# Notebook 3 · Economía, distribuciones y perfiles de consumo — Electro Puno S.A.A.

Reúne tres partes:
* **Parte A — Economía y tarifas:** ¿qué tarifas facturan y consumen más? ¿cómo se relacionan consumo y facturación?
* **Parte B — Distribuciones y valores atípicos:** forma de las distribuciones, ceros, negativos, ajuste de distribuciones teóricas, casos extremos.
* **Parte C — Perfiles mediante clustering:** ¿se pueden agrupar suministros u otras unidades comparables?

Termina con un **resumen ejecutivo integrado** (temporal + geográfico + económico + distribuciones + perfiles).

**Es independiente:** no necesita que se hayan ejecutado los otros notebooks. **Requisitos:** `pip install duckdb pandas numpy plotly scipy scikit-learn`.

> **Unidades.** *Suministro‑mes* = un suministro observado en un mes (2023–2025: una fila; 2026: se suma `clientes`). Las **distribuciones, medianas y clustering usan solo 2023–2025** (detalle individual). 2026 (agregado por grupos) se usa únicamente para totales y conteos.

In [2]:
# ============================================================
# CONFIGURACIÓN COMÚN (idéntica en los tres notebooks)
# Qué hace: importa librerías, localiza la raíz del proyecto,
# comprueba que existan los archivos y abre DuckDB.
# ============================================================
import sys, json, hashlib, warnings
from pathlib import Path
import numpy as np
import pandas as pd
from IPython.display import display

warnings.filterwarnings("ignore", category=FutureWarning)

def verificar_paquetes(requeridos):
    """requeridos: {nombre_del_módulo: nombre_en_pip}"""
    import importlib
    faltan = []
    for modulo, paquete in requeridos.items():
        try:
            importlib.import_module(modulo)
        except ImportError:
            faltan.append(paquete)
    if faltan:
        raise ImportError(
            "Faltan paquetes en el entorno de este kernel: " + ", ".join(faltan)
            + "\nInstálalos con:\n    pip install " + " ".join(faltan)
            + "\ny reinicia el kernel."
        )

verificar_paquetes({'duckdb': 'duckdb', 'pandas': 'pandas', 'numpy': 'numpy', 'plotly': 'plotly', 'scipy': 'scipy', 'sklearn': 'scikit-learn'})

import duckdb
import plotly.express as px
import plotly.graph_objects as go
import plotly.io as pio
from plotly.subplots import make_subplots
from scipy import stats
from sklearn.preprocessing import StandardScaler
from sklearn.cluster import KMeans
from sklearn.metrics import silhouette_score, calinski_harabasz_score, davies_bouldin_score, adjusted_rand_score
from sklearn.decomposition import PCA
pio.templates.default = "plotly_white"
pd.set_option("display.max_columns", 40)
pd.set_option("display.width", 200)
pd.set_option("display.float_format", lambda x: f"{x:,.2f}")

# ---------- 1) Localizar la raíz del proyecto (robusto en VS Code) ----------
def encontrar_raiz():
    """Busca hacia arriba (y un nivel hacia abajo) la carpeta que contiene
    preprocesamiento/silver. Sirve aunque el directorio de trabajo cambie."""
    inicios = [Path.cwd().resolve()]
    ruta_nb = globals().get("__vsc_ipynb_file__")      # VS Code define esta variable
    if ruta_nb:
        inicios.insert(0, Path(ruta_nb).resolve().parent)
    for inicio in inicios:
        for base in [inicio, *inicio.parents]:
            if (base / "preprocesamiento" / "silver").is_dir():
                return base
        for hijo in inicio.glob("*/preprocesamiento/silver"):
            return hijo.parent.parent
    raise FileNotFoundError(
        "No encuentro la carpeta 'preprocesamiento/silver'.\n"
        f"Directorio de trabajo actual: {Path.cwd()}\n"
        "Abre VS Code en la carpeta 'visualizacion-datos-trabajo' (o dentro de ella) "
        "y vuelve a ejecutar."
    )

RAIZ = encontrar_raiz()
SILVER = RAIZ / "preprocesamiento" / "silver"
RESULTADOS = RAIZ / "analisis" / "resultados"      # resultados intermedios (no son los datos originales)
RESULTADOS.mkdir(parents=True, exist_ok=True)

ARCHIVOS = {
    "clientes":   SILVER / "consumo_clientes.parquet",
    "agregado":   SILVER / "consumo_agregado.parquet",
    "resumen":    SILVER / "resumen_mensual.parquet",
    "rechazados": SILVER / "_rechazados.parquet",
}
OPCIONALES = {"rechazados"}
for nombre, ruta in ARCHIVOS.items():
    if not ruta.exists():
        if nombre in OPCIONALES:
            print(f"⚠️  Archivo opcional no encontrado: {ruta.name}")
        else:
            raise FileNotFoundError(f"Falta el archivo obligatorio: {ruta}")

# ---------- 2) Conexión DuckDB y vistas (no se carga nada en memoria) ----------
con = duckdb.connect()
con.execute("SET preserve_insertion_order = false")   # menos memoria en agregaciones grandes

def _lit(ruta):                                       # escapa comillas simples para SQL
    return str(ruta.as_posix()).replace("'", "''")

for nombre, ruta in ARCHIVOS.items():
    if ruta.exists():
        con.execute(f"CREATE OR REPLACE VIEW {nombre} AS SELECT * FROM read_parquet('{_lit(ruta)}')")

def q(sql):
    """Ejecuta SQL en DuckDB y devuelve un DataFrame de pandas."""
    return con.execute(sql).df()

def sql_lista(valores):
    """Convierte una lista de textos en ('A','B') seguro para SQL."""
    if len(valores) == 0:
        return "(NULL)"
    return "(" + ", ".join("'" + str(v).replace("'", "''") + "'" for v in valores) + ")"

# ---------- 3) Validación de columnas ----------
COLUMNAS_OBLIGATORIAS = {
    "clientes": ["codigo_cliente","ubigeo","departamento","provincia","distrito","tarifa",
                 "periodo","fecha_alta","consumo_kwh","facturacion_soles"],
    "agregado": ["ubigeo","departamento","provincia","distrito","tarifa","periodo",
                 "consumo_kwh","facturacion_soles","clientes"],
    "resumen":  ["periodo","anio","mes","granularidad","n_suministros",
                 "consumo_kwh_total","facturacion_soles_total","consumo_kwh_promedio"],
}
for nombre, cols in COLUMNAS_OBLIGATORIAS.items():
    existentes = set(q(f"DESCRIBE SELECT * FROM {nombre}")["column_name"])
    faltan = [c for c in cols if c not in existentes]
    if faltan:
        raise KeyError(f"En '{ARCHIVOS[nombre].name}' faltan las columnas: {faltan}. "
                       f"Columnas encontradas: {sorted(existentes)}")

# ---------- 4) Huella de los datos (para reutilizar resultados guardados) ----------
HUELLA = hashlib.md5("|".join(
    f"{p.name}:{p.stat().st_size}:{p.stat().st_mtime_ns}" for p in ARCHIVOS.values() if p.exists()
).encode()).hexdigest()[:8]

def cachear(nombre, sql):
    """Si ya existe el resultado guardado con la misma huella de datos, lo lee;
    si no, ejecuta la consulta y lo guarda en analisis/resultados/ (Parquet)."""
    ruta = RESULTADOS / f"nb03_{nombre}_{HUELLA}.parquet"
    if ruta.exists():
        return con.execute(f"SELECT * FROM read_parquet('{_lit(ruta)}')").df()
    for viejo in RESULTADOS.glob(f"nb03_{nombre}_*.parquet"):
        viejo.unlink()                                 # elimina versiones obsoletas
    df = q(sql)
    con.register("_tmp_cache", df)
    con.execute(f"COPY _tmp_cache TO '{_lit(ruta)}' (FORMAT PARQUET)")
    con.unregister("_tmp_cache")
    return df

# ---------- 5) Constantes y utilidades compartidas ----------
SEMILLA = 42                                           # semilla para todo muestreo
MESES = ["Ene","Feb","Mar","Abr","May","Jun","Jul","Ago","Sep","Oct","Nov","Dic"]
COLOR_DETALLE  = "#1f77b4"    # azul: 2023-2025 (detalle por suministro)
COLOR_AGREGADO = "#ff7f0e"    # naranja: 2026 (agregado)
COLOR_CONSUMO  = "#2ca02c"    # verde: consumo (kWh)
COLOR_FACTURA  = "#d62728"    # rojo: facturación (S/)
# Fecha de alta <= este valor se trata como "dudosa" (valor por defecto/centinela probable).
FECHA_ALTA_DUDOSA_HASTA = "1989-01-01"

def fmt_n(x, d=0):
    return "s/d" if pd.isna(x) else f"{x:,.{d}f}"

def fmt_pct(x, d=1):
    return "s/d" if pd.isna(x) else f"{x:+.{d}f}%"

print(f"Raíz del proyecto : {RAIZ}")
print(f"Carpeta silver    : {SILVER}")
print(f"Resultados        : {RESULTADOS}")
print(f"Huella de datos   : {HUELLA}")
print("Archivos: " + ", ".join(f"{n} ({p.stat().st_size/1e6:,.1f} MB)" for n, p in ARCHIVOS.items() if p.exists()))

Raíz del proyecto : D:\PROYECTO\visualizacion-datos-trabajo
Carpeta silver    : D:\PROYECTO\visualizacion-datos-trabajo\preprocesamiento\silver
Resultados        : D:\PROYECTO\visualizacion-datos-trabajo\analisis\resultados
Huella de datos   : 222a6326
Archivos: clientes (100.1 MB), agregado (0.6 MB), resumen (0.0 MB), rechazados (0.0 MB)


## 0. Revisión previa: unidades, calidad y tarifas

Antes de calcular, comprobamos qué representa cada archivo y qué problemas de calidad afectan a los indicadores económicos.

In [3]:
n_cli = con.execute("SELECT COUNT(*) FROM clientes").fetchone()[0]
n_agr = con.execute("SELECT COUNT(*) FROM agregado").fetchone()[0]
print(f"consumo_clientes: {n_cli:,} filas (suministro-mes) | consumo_agregado: {n_agr:,} filas (grupos; ver columna `clientes`)")
print("Columnas de clientes:", ", ".join(q("DESCRIBE SELECT * FROM clientes")["column_name"]))
print("Columnas de agregado:", ", ".join(q("DESCRIBE SELECT * FROM agregado")["column_name"]))

# --- Nulos y valores especiales (solo detalle) ---
cal = q("""SELECT COUNT(*)::BIGINT AS filas,
  SUM(CASE WHEN consumo_kwh IS NULL THEN 1 ELSE 0 END)::BIGINT AS kwh_nulo,
  SUM(CASE WHEN facturacion_soles IS NULL THEN 1 ELSE 0 END)::BIGINT AS fact_nula,
  SUM(CASE WHEN consumo_kwh < 0 THEN 1 ELSE 0 END)::BIGINT AS kwh_negativo,
  SUM(CASE WHEN consumo_kwh = 0 THEN 1 ELSE 0 END)::BIGINT AS kwh_cero,
  SUM(CASE WHEN facturacion_soles < 0 THEN 1 ELSE 0 END)::BIGINT AS fact_negativa,
  SUM(CASE WHEN facturacion_soles = 0 THEN 1 ELSE 0 END)::BIGINT AS fact_cero,
  SUM(CASE WHEN consumo_kwh > 0 AND facturacion_soles = 0 THEN 1 ELSE 0 END)::BIGINT AS kwh_pos_fact_cero,
  SUM(CASE WHEN consumo_kwh = 0 AND facturacion_soles > 0 THEN 1 ELSE 0 END)::BIGINT AS kwh_cero_fact_pos
FROM clientes""").iloc[0]
print("\nValores especiales en consumo_clientes:")
display(pd.DataFrame({"filas": cal, "% del total": 100 * cal / cal["filas"]}).style.format({"filas": "{:,.0f}", "% del total": "{:.2f}"}))
print("Nota: los consumos negativos, si existían en el origen, no aparecen en esta capa silver; sí hay FACTURACIÓN negativa (ajustes/regularizaciones probables).")
print("      kWh = 0 con facturación positiva es compatible con cargos fijos; no se interpreta como error.")

# --- Fechas de alta: ¿hay valores por defecto? ---
top_alta = q("SELECT fecha_alta, COUNT(*)::BIGINT AS filas FROM clientes GROUP BY 1 ORDER BY filas DESC LIMIT 8")
top_alta["% del total"] = 100 * top_alta["filas"] / n_cli
print("\nFechas de alta más frecuentes (las repetidas masivamente sugieren valores por defecto):")
display(top_alta.style.format({"filas": "{:,.0f}", "% del total": "{:.2f}"}))
dud = con.execute(f"SELECT COUNT(*) FROM clientes WHERE fecha_alta <= DATE '{FECHA_ALTA_DUDOSA_HASTA}'").fetchone()[0]
print(f"Filas con fecha_alta <= {FECHA_ALTA_DUDOSA_HASTA} (tratadas como 'dudosas' para calcular antigüedad): {dud:,} ({100*dud/n_cli:.1f}%)")

consumo_clientes: 11,432,753 filas (suministro-mes) | consumo_agregado: 74,485 filas (grupos; ver columna `clientes`)
Columnas de clientes: codigo_cliente, ubigeo, departamento, provincia, distrito, tarifa, estado_cliente, periodo, fecha_alta, consumo_kwh, facturacion_soles, fecha_corte, clientes, granularidad, source_file
Columnas de agregado: codigo_cliente, ubigeo, departamento, provincia, distrito, tarifa, estado_cliente, periodo, fecha_alta, consumo_kwh, facturacion_soles, fecha_corte, clientes, granularidad, source_file

Valores especiales en consumo_clientes:


,filas,% del total
filas,"11,432,753",100.00
kwh_nulo,0,0.00
fact_nula,0,0.00
kwh_negativo,0,0.00
kwh_cero,"1,960,944",17.15
fact_negativa,"18,767",0.16
fact_cero,"170,506",1.49
kwh_pos_fact_cero,"109,738",0.96
kwh_cero_fact_pos,"1,893,102",16.56


Nota: los consumos negativos, si existían en el origen, no aparecen en esta capa silver; sí hay FACTURACIÓN negativa (ajustes/regularizaciones probables).
      kWh = 0 con facturación positiva es compatible con cargos fijos; no se interpreta como error.

Fechas de alta más frecuentes (las repetidas masivamente sugieren valores por defecto):


,fecha_alta,filas,% del total
0,1989-01-01 00:00:00,"630,310",5.51
1,2008-01-11 00:00:00,"170,617",1.49
2,1980-01-01 00:00:00,"140,137",1.23
3,2004-11-26 00:00:00,"119,759",1.05
4,2007-01-11 00:00:00,"118,435",1.04
5,2009-01-05 00:00:00,"114,644",1.00
6,2009-01-11 00:00:00,"74,751",0.65
7,1992-01-04 00:00:00,"59,646",0.52


Filas con fecha_alta <= 1989-01-01 (tratadas como 'dudosas' para calcular antigüedad): 866,323 (7.6%)


In [4]:
# --- Resumen por tarifa (detalle + agregado): base común de la Parte A ---
tar_tot = cachear("tarifa_total", """
SELECT tarifa, SUM(suministros_mes)::BIGINT AS suministros_mes, SUM(kwh) AS kwh, SUM(fact) AS fact, SUM(n_cero)::BIGINT AS n_kwh_cero
FROM (
  SELECT tarifa, COUNT(*) AS suministros_mes, SUM(consumo_kwh) AS kwh, SUM(facturacion_soles) AS fact,
         SUM(CASE WHEN consumo_kwh = 0 THEN 1 ELSE 0 END) AS n_cero FROM clientes GROUP BY 1
  UNION ALL
  SELECT tarifa, SUM(clientes), SUM(consumo_kwh), SUM(facturacion_soles),
         SUM(CASE WHEN consumo_kwh = 0 THEN clientes ELSE 0 END) FROM agregado GROUP BY 1)
GROUP BY 1
""").set_index("tarifa")
tar_tot["pct_kwh_cero"] = 100 * tar_tot["n_kwh_cero"] / tar_tot["suministros_mes"]
TARIFAS_SIN_KWH = tar_tot.index[tar_tot["pct_kwh_cero"] >= 99.0].tolist()
TARIFAS_CON_KWH = [t for t in tar_tot.sort_values("fact", ascending=False).index if t not in TARIFAS_SIN_KWH]
TARIFAS_ORDEN = tar_tot.sort_values("fact", ascending=False).index.tolist()
print("Tarifas SIN kWh informado (≥99 % de filas con kWh = 0):", TARIFAS_SIN_KWH)
print("Tarifas con kWh informado:", TARIFAS_CON_KWH)
print("→ Para esas tarifas se analiza la facturación, pero NO su consumo ni S/kWh (el consumo no está medido en estos archivos).")
PALETA_TAR = {t: px.colors.qualitative.Safe[i % len(px.colors.qualitative.Safe)] for i, t in enumerate(TARIFAS_ORDEN)}

# Muestreo reproducible: se decide por un hash determinista (no depende de hilos ni orden).
def sql_hash_u(sal=SEMILLA):
    return f"(hash(CAST(codigo_cliente AS VARCHAR) || '-' || ubigeo || '-' || CAST(periodo AS VARCHAR) || '-{sal}') % 1000000)"

Tarifas SIN kWh informado (≥99 % de filas con kWh = 0): ['BT3', 'MT3', 'BT5A', 'MT2', 'BT2']
Tarifas con kWh informado: ['BT5B', 'MT4', 'BT5D', 'BT4', 'BT6']
→ Para esas tarifas se analiza la facturación, pero NO su consumo ni S/kWh (el consumo no está medido en estos archivos).


# PARTE A · Análisis económico y tarifario

## A1. Facturación y consumo total por tarifa (preguntas 1, 2 y 5)

**Indicadores:** total de S/ y kWh por tarifa, participación %, suministros‑mes, y *facturación promedio por suministro‑mes* (= S/ totales ÷ suministros‑mes). El **total** mide tamaño económico de la tarifa; el **promedio** mide cuánto aporta cada unidad: son preguntas distintas.
**Gráficos:** barras interactivas. Las tarifas **sin kWh informado** aparecen en gris en el gráfico de consumo (su consumo no está medido).

In [5]:
t = tar_tot.loc[TARIFAS_ORDEN].copy()
t["part_fact"] = 100 * t["fact"] / t["fact"].sum()
t["part_kwh"]  = 100 * t["kwh"] / t["kwh"].sum()
t["soles_por_suministro"] = t["fact"] / t["suministros_mes"]
t["kwh_por_suministro"] = np.where(t.index.isin(TARIFAS_SIN_KWH), np.nan, t["kwh"] / t["suministros_mes"])
t["soles_por_kwh"] = np.where(t.index.isin(TARIFAS_SIN_KWH), np.nan, t["fact"] / t["kwh"].replace(0, np.nan))
display(t[["suministros_mes", "kwh", "fact", "part_kwh", "part_fact", "kwh_por_suministro", "soles_por_suministro", "soles_por_kwh"]]
        .rename(columns={"part_kwh": "% consumo", "part_fact": "% facturación", "kwh_por_suministro": "kWh/suministro-mes",
                         "soles_por_suministro": "S//suministro-mes", "soles_por_kwh": "S/ por kWh (razón observada)"})
        .style.format({"suministros_mes": "{:,.0f}", "kwh": "{:,.0f}", "fact": "{:,.0f}", "% consumo": "{:.1f}", "% facturación": "{:.1f}",
                       "kWh/suministro-mes": "{:.1f}", "S//suministro-mes": "{:.1f}", "S/ por kWh (razón observada)": "{:.3f}"}, na_rep="no informado"))

fig = make_subplots(rows=1, cols=2, subplot_titles=("Facturación total por tarifa (S/)", "Consumo total por tarifa (kWh)"), horizontal_spacing=0.14)
fig.add_trace(go.Bar(x=t.index, y=t["fact"], marker_color=[PALETA_TAR[x] for x in t.index], customdata=np.stack([t["part_fact"], t["suministros_mes"]], axis=1),
                     hovertemplate="<b>%{x}</b><br>S/ %{y:,.0f}<br>%{customdata[0]:.1f}% de la facturación<br>Suministros-mes: %{customdata[1]:,.0f}<extra></extra>", showlegend=False), row=1, col=1)
col_k = ["lightgray" if x in TARIFAS_SIN_KWH else COLOR_CONSUMO for x in t.index]
fig.add_trace(go.Bar(x=t.index, y=t["kwh"], marker_color=col_k, customdata=np.stack([t["part_kwh"], t["pct_kwh_cero"]], axis=1),
                     hovertemplate="<b>%{x}</b><br>%{y:,.0f} kWh<br>%{customdata[0]:.1f}% del consumo informado<br>Filas con kWh = 0: %{customdata[1]:.1f}%<extra></extra>", showlegend=False), row=1, col=2)
fig.update_yaxes(title_text="Soles (S/)", tickformat=",.0f", row=1, col=1); fig.update_yaxes(title_text="kWh", tickformat=",.0f", row=1, col=2)
fig.update_xaxes(title_text="Tarifa")
fig.update_layout(title="Totales por tarifa (gris = kWh no informado en los archivos)", height=470)
fig.show()

,suministros_mes,kwh,fact,% consumo,% facturación,kWh/suministro-mes,S//suministro-mes,S/ por kWh (razón observada)
tarifa,,,,,,,,
BT5B,"14,182,726","686,587,028","782,461,076",77.3,66.4,48.4,55.2,1.140
MT4,"25,326","133,785,531","169,012,302",15.1,14.4,5282.5,6673.5,1.263
MT2,"12,328",0,"110,519,130",0.0,9.4,no informado,8964.9,no informado
MT3,"7,999",0,"70,569,475",0.0,6.0,no informado,8822.3,no informado
BT5D,"80,925","57,423,657","29,818,453",6.5,2.5,709.6,368.5,0.519
BT4,"1,725","6,555,598","7,056,664",0.7,0.6,3800.3,4090.8,1.076
BT6,"12,138","3,588,603","4,491,665",0.4,0.4,295.7,370.0,1.252
BT3,658,0,"2,217,212",0.0,0.2,no informado,3369.6,no informado
BT5A,563,0,"899,443",0.0,0.1,no informado,1597.6,no informado


## A2. Promedios por unidad comparable (preguntas 3 y 5)

**Unidad comparable:** suministro‑mes. **Indicadores:** consumo **promedio** (todas las etapas) y **mediano** (solo detalle 2023–2025) por suministro‑mes; facturación promedio por suministro‑mes.
**Cómo leerlo:** si la media es mucho mayor que la mediana, unos pocos suministros grandes arrastran el promedio (distribución asimétrica, Parte B).
**Limitación:** la mediana solo existe para 2023–2025; promedios con tarifas sin kWh no se calculan.

In [6]:
tar_det = cachear("tarifa_detalle", """
SELECT tarifa, COUNT(*)::BIGINT AS n, AVG(consumo_kwh) AS kwh_media, median(consumo_kwh) AS kwh_mediana,
       quantile_cont(consumo_kwh, 0.25) AS kwh_p25, quantile_cont(consumo_kwh, 0.75) AS kwh_p75,
       median(CASE WHEN consumo_kwh > 0 THEN consumo_kwh END) AS kwh_mediana_pos,
       AVG(facturacion_soles) AS fact_media, median(facturacion_soles) AS fact_mediana,
       SUM(CASE WHEN facturacion_soles < 0 THEN 1 ELSE 0 END)::BIGINT AS n_fact_neg,
       SUM(CASE WHEN consumo_kwh > 0 AND facturacion_soles = 0 THEN 1 ELSE 0 END)::BIGINT AS n_kwh_pos_fact_cero,
       SUM(CASE WHEN consumo_kwh = 0 AND facturacion_soles > 0 THEN 1 ELSE 0 END)::BIGINT AS n_kwh_cero_fact_pos
FROM clientes GROUP BY 1
""").set_index("tarifa").reindex(TARIFAS_ORDEN)

comp = tar_det.join(t[["kwh_por_suministro", "soles_por_suministro"]])
con_k = [x for x in TARIFAS_ORDEN if x in TARIFAS_CON_KWH]

fig = make_subplots(rows=1, cols=2, subplot_titles=("Consumo por suministro-mes (tarifas con kWh informado)", "Facturación por suministro-mes (todas las tarifas)"), horizontal_spacing=0.12)
fig.add_trace(go.Bar(x=con_k, y=comp.loc[con_k, "kwh_media"], name="Media 2023–2025", marker_color=COLOR_DETALLE,
                     hovertemplate="<b>%{x}</b><br>Media: %{y:,.1f} kWh<extra></extra>"), row=1, col=1)
fig.add_trace(go.Bar(x=con_k, y=comp.loc[con_k, "kwh_mediana"], name="Mediana 2023–2025", marker_color="#17becf",
                     hovertemplate="<b>%{x}</b><br>Mediana: %{y:,.1f} kWh<extra></extra>"), row=1, col=1)
fig.add_trace(go.Bar(x=con_k, y=comp.loc[con_k, "kwh_por_suministro"], name="Media 2023–2026 (incl. agregado)", marker_color=COLOR_AGREGADO,
                     hovertemplate="<b>%{x}</b><br>Media 2023–2026: %{y:,.1f} kWh<extra></extra>"), row=1, col=1)
fig.add_trace(go.Bar(x=TARIFAS_ORDEN, y=comp["fact_media"], name="Media 2023–2025 (S/)", marker_color=COLOR_FACTURA,
                     hovertemplate="<b>%{x}</b><br>Media: S/ %{y:,.1f}<extra></extra>"), row=1, col=2)
fig.add_trace(go.Bar(x=TARIFAS_ORDEN, y=comp["fact_mediana"], name="Mediana 2023–2025 (S/)", marker_color="#e377c2",
                     hovertemplate="<b>%{x}</b><br>Mediana: S/ %{y:,.1f}<extra></extra>"), row=1, col=2)
fig.update_yaxes(title_text="kWh por suministro-mes", type="log", row=1, col=1); fig.update_yaxes(title_text="S/ por suministro-mes", type="log", row=1, col=2)
fig.update_xaxes(title_text="Tarifa"); fig.update_layout(barmode="group", height=480, legend=dict(orientation="h", y=-0.25),
                                                        title="Promedios y medianas por unidad comparable (eje logarítmico)")
fig.show()
print("Nota: eje Y logarítmico porque las tarifas de media tensión superan en órdenes de magnitud a las residenciales.")

FloatProgress(value=0.0, layout=Layout(width='auto'), style=ProgressStyle(bar_color='black'))

Nota: eje Y logarítmico porque las tarifas de media tensión superan en órdenes de magnitud a las residenciales.


## A3. Segmentos con comportamientos económicos distintos (pregunta 6)

**Indicadores por tarifa:** kWh promedio y S/ promedio por suministro‑mes, y la **razón S/kWh** (facturación ÷ consumo): *razón observada, no tarifa contractual*; incluye cargos fijos, ajustes y mezcla de bloques.
**Gráficos:** (1) burbujas por tarifa; (2) mapa de calor de S/kWh por tarifa × provincia, para ver si el mismo tipo de tarifa se comporta distinto según el territorio.
**Limitación:** el mapa de calor excluye celdas con menos de 500 suministros‑mes.

In [7]:
tb = t.loc[[x for x in TARIFAS_ORDEN if x in TARIFAS_CON_KWH]].reset_index()
fig = px.scatter(tb, x="kwh_por_suministro", y="soles_por_suministro", size="suministros_mes", color="tarifa", color_discrete_map=PALETA_TAR,
                 log_x=True, log_y=True, size_max=55, hover_name="tarifa",
                 hover_data={"kwh_por_suministro": ":,.1f", "soles_por_suministro": ":,.1f", "soles_por_kwh": ":.3f", "suministros_mes": ":,.0f", "part_fact": ":.1f", "tarifa": False},
                 labels={"kwh_por_suministro": "kWh por suministro-mes (log)", "soles_por_suministro": "S/ por suministro-mes (log)",
                         "soles_por_kwh": "S/ por kWh", "suministros_mes": "Suministros-mes", "part_fact": "% de la facturación"})
fig.update_layout(title="Segmentos tarifarios: consumo vs. facturación por suministro-mes (tamaño = suministros-mes)", height=500)
fig.show()

tp = cachear("tarifa_provincia", """
SELECT tarifa, provincia, SUM(s)::BIGINT AS suministros_mes, SUM(kwh) AS kwh, SUM(fact) AS fact FROM (
  SELECT tarifa, provincia, COUNT(*) AS s, SUM(consumo_kwh) AS kwh, SUM(facturacion_soles) AS fact FROM clientes WHERE departamento = 'PUNO' GROUP BY 1, 2
  UNION ALL
  SELECT tarifa, provincia, SUM(clientes), SUM(consumo_kwh), SUM(facturacion_soles) FROM agregado WHERE departamento = 'PUNO' GROUP BY 1, 2) GROUP BY 1, 2
""")
tpk = tp[tp["tarifa"].isin(TARIFAS_CON_KWH) & (tp["suministros_mes"] >= 500) & (tp["kwh"] > 0)].copy()
tpk["soles_por_kwh"] = tpk["fact"] / tpk["kwh"]
hm = tpk.pivot(index="provincia", columns="tarifa", values="soles_por_kwh")
cnt = tpk.pivot(index="provincia", columns="tarifa", values="suministros_mes")
fig = go.Figure(go.Heatmap(z=hm.values, x=hm.columns, y=hm.index, colorscale="YlOrRd", customdata=cnt.values,
                           colorbar=dict(title="S/ por kWh"), hovertemplate="Provincia: %{y}<br>Tarifa: %{x}<br>%{z:.3f} S/kWh<br>Suministros-mes: %{customdata:,.0f}<extra></extra>"))
fig.update_layout(title="Razón facturación/kWh observada por tarifa y provincia (celdas con ≥500 suministros-mes)", xaxis_title="Tarifa", yaxis_title="Provincia", height=480)
fig.show()

## A4. Relación entre consumo y facturación (pregunta 4)

**Método:** tomamos una **muestra estratificada reproducible** del detalle 2023–2025: hasta 40 000 filas por tarifa (todas las filas si la tarifa es más pequeña), seleccionadas con un hash determinista con semilla 42. Cada fila lleva su `peso` (inverso de la tasa de muestreo) por si se quisieran estimaciones poblacionales.
**Indicadores:** correlaciones de Pearson (sensible a extremos) y de Spearman (por rangos), y pendiente log‑log (elasticidad aproximada: cuánto crece S/ cuando el kWh crece 1 %) — solo con consumo y facturación **positivos**.
**Gráfico:** dispersión consumo vs. facturación (log‑log).
**Limitación:** la muestra es estratificada, no proporcional; se usa para *formas* y *relaciones*, no para totales (los totales salen exactos de SQL).

In [8]:
N_MUESTRA = 40000
n_t = q("SELECT tarifa, COUNT(*)::BIGINT AS n FROM clientes GROUP BY 1").set_index("tarifa")["n"]
tasa = (N_MUESTRA / n_t).clip(upper=1.0)
caso = " ".join(f"WHEN '{k}' THEN {int(v * 1000000)}" for k, v in tasa.items())
muestra = cachear("muestra_estratificada", f"""
SELECT periodo, provincia, distrito, tarifa, fecha_alta, consumo_kwh, facturacion_soles
FROM clientes
WHERE {sql_hash_u()} < (CASE tarifa {caso} ELSE 1000000 END)
""")
muestra["peso"] = muestra["tarifa"].map(1 / tasa)
print(f"Muestra estratificada: {len(muestra):,} filas (semilla {SEMILLA}). Filas por tarifa:")
display(muestra.groupby("tarifa").size().reindex(TARIFAS_ORDEN).to_frame("filas en la muestra").T)

pos = muestra[(muestra["consumo_kwh"] > 0) & (muestra["facturacion_soles"] > 0)].copy()
filas = []
for nombre, sub in [("Todas las tarifas (muestra)", pos)] + [(x, pos[pos["tarifa"] == x]) for x in TARIFAS_CON_KWH]:
    if len(sub) < 30: continue
    lx, ly = np.log(sub["consumo_kwh"]), np.log(sub["facturacion_soles"])
    sl = stats.linregress(lx, ly)
    filas.append({"segmento": nombre, "n": len(sub), "Pearson": np.corrcoef(sub["consumo_kwh"], sub["facturacion_soles"])[0, 1],
                  "Spearman": stats.spearmanr(sub["consumo_kwh"], sub["facturacion_soles"])[0], "pendiente log-log": sl.slope, "R² log-log": sl.rvalue ** 2})
corr_tab = pd.DataFrame(filas).set_index("segmento")
display(corr_tab.style.format({"n": "{:,.0f}", "Pearson": "{:.3f}", "Spearman": "{:.3f}", "pendiente log-log": "{:.3f}", "R² log-log": "{:.3f}"}))
print("Lectura: Spearman alto = a más kWh, más soles (relación monótona). Pendiente log-log < 1 → la facturación crece menos que proporcionalmente (cargos fijos pesan más en consumos bajos).")

vis = pos.sample(min(60000, len(pos)), random_state=SEMILLA)
fig = px.scatter(vis, x="consumo_kwh", y="facturacion_soles", color="tarifa", color_discrete_map=PALETA_TAR, log_x=True, log_y=True, opacity=0.45,
                 render_mode="webgl", hover_data={"provincia": True, "distrito": True, "periodo": True, "consumo_kwh": ":,.1f", "facturacion_soles": ":,.1f"},
                 labels={"consumo_kwh": "Consumo (kWh, escala log)", "facturacion_soles": "Facturación (S/, escala log)", "tarifa": "Tarifa"})
fig.update_layout(title=f"Consumo vs. facturación por suministro-mes (muestra de {len(vis):,} filas con valores positivos)", height=560)
fig.show()

Muestra estratificada: 128,973 filas (semilla 42). Filas por tarifa:


tarifa,BT5B,MT4,MT2,MT3,BT5D,BT4,BT6,BT3,BT5A,BT2
filas en la muestra,40201,20497,9929,6347,39740,1397,9775,514,459,114


,n,Pearson,Spearman,pendiente log-log,R² log-log
segmento,,,,,
Todas las tarifas (muestra),"97,405",0.622,0.945,0.822,0.866
BT5B,"32,980",0.963,0.962,0.704,0.818
MT4,"17,486",0.623,0.930,0.738,0.841
BT5D,"36,272",0.481,0.985,0.900,0.925
BT4,"1,304",0.803,0.940,0.582,0.758
BT6,"9,363",0.749,0.979,0.895,0.987


Lectura: Spearman alto = a más kWh, más soles (relación monótona). Pendiente log-log < 1 → la facturación crece menos que proporcionalmente (cargos fijos pesan más en consumos bajos).


# PARTE B · Distribuciones estadísticas y valores atípicos

Se analizan `consumo_kwh` y `facturacion_soles` del **detalle 2023–2025** (2026 es agregado y no tiene valores individuales). Las estadísticas se calculan **exactas en DuckDB sobre todas las filas**; solo los gráficos de forma y los ajustes usan la muestra reproducible de la sección A4.

## B1. Estadísticos descriptivos

**Indicadores:** media, mediana, desviación estándar, percentiles, asimetría y curtosis (exceso: 0 = normal). Se calculan sobre subconjuntos **declarados explícitamente** (todas las filas, solo valores positivos, solo BT5B).
**Cómo leerlo:** asimetría > 1 = cola derecha larga; curtosis de exceso muy alta = valores extremos mucho más frecuentes que en una normal; media ≫ mediana = pocos suministros grandes arrastran el promedio.

In [9]:
SUBCONJUNTOS = [
    ("Consumo kWh · todas las filas", "consumo_kwh", "TRUE"),
    ("Consumo kWh · solo > 0 (tarifas con kWh)", "consumo_kwh", f"consumo_kwh > 0 AND tarifa IN {sql_lista(TARIFAS_CON_KWH)}"),
    ("Consumo kWh · solo > 0, BT5B", "consumo_kwh", "consumo_kwh > 0 AND tarifa = 'BT5B'"),
    ("Facturación S/ · todas las filas", "facturacion_soles", "TRUE"),
    ("Facturación S/ · solo > 0", "facturacion_soles", "facturacion_soles > 0"),
    ("Facturación S/ · solo > 0, BT5B", "facturacion_soles", "facturacion_soles > 0 AND tarifa = 'BT5B'"),
]
PCTS = [0.01, 0.05, 0.25, 0.5, 0.75, 0.95, 0.99, 0.999]
def sql_stats(etq, col, where):
    p = ", ".join(f"quantile_cont({col}, {x}) AS p{int(x * 1000):04d}" for x in PCTS)
    return (f"SELECT '{etq}' AS subconjunto, COUNT(*)::BIGINT AS n, AVG({col}) AS media, STDDEV_SAMP({col}) AS desv_est, MIN({col}) AS minimo, {p}, "
            f"MAX({col}) AS maximo, SKEWNESS({col}) AS asimetria, KURTOSIS({col}) AS curtosis_exceso FROM clientes WHERE {where}")
est = cachear("estadisticos", " UNION ALL ".join(sql_stats(*s) for s in SUBCONJUNTOS)).set_index("subconjunto")
est = est.rename(columns={f"p{int(x*1000):04d}": f"P{x*100:g}" for x in PCTS})
est["CV (%)"] = 100 * est["desv_est"] / est["media"]
display(est.T.style.format("{:,.2f}"))

FloatProgress(value=0.0, layout=Layout(width='auto'), style=ProgressStyle(bar_color='black'))

subconjunto,Consumo kWh · todas las filas,Consumo kWh · solo > 0 (tarifas con kWh),"Consumo kWh · solo > 0, BT5B",Facturación S/ · todas las filas,Facturación S/ · solo > 0,"Facturación S/ · solo > 0, BT5B"
n,"11,432,753.00","9,471,809.00","9,378,801.00","11,432,753.00","11,243,480.00","11,134,610.00"
media,61.17,73.83,57.67,81.32,82.71,55.80
desv_est,"1,109.16","1,218.19",186.05,"3,934.93","3,967.85",220.08
minimo,0.00,0.01,0.10,"-60,645.40",0.10,0.10
P1,0.00,1.00,1.00,0.00,4.90,4.90
P5,0.00,1.00,1.00,5.80,6.20,6.20
P25,2.00,7.00,7.00,8.30,8.40,8.40
P50,15.00,23.00,23.00,15.80,16.20,16.00
P75,49.00,60.00,58.00,51.40,52.40,51.20
P95,166.00,190.00,174.00,191.30,193.50,182.10


## B2. Ceros, negativos y casos de facturación inusual

**Qué se mide:** frecuencia de `kWh = 0`, facturación negativa, y los dos cruces relevantes: *kWh > 0 con facturación 0* y *kWh = 0 con facturación > 0*.
**Cómo interpretarlos (sin juzgar):** la facturación negativa puede ser ajuste o regularización; *kWh = 0 con facturación positiva* es compatible con cargos fijos o consumo no medido; *kWh > 0 con facturación 0* podría ser exoneración, refacturación, medición pendiente u otra causa: se **señala, no se califica**.

In [10]:
zn = tar_det[["n", "n_fact_neg", "n_kwh_pos_fact_cero", "n_kwh_cero_fact_pos"]].copy()
for c_ in ["n_fact_neg", "n_kwh_pos_fact_cero", "n_kwh_cero_fact_pos"]:
    zn["% " + c_] = 100 * zn[c_] / zn["n"]
zn.loc["TOTAL"] = [zn["n"].sum(), zn["n_fact_neg"].sum(), zn["n_kwh_pos_fact_cero"].sum(), zn["n_kwh_cero_fact_pos"].sum(), np.nan, np.nan, np.nan]
zn.loc["TOTAL", ["% n_fact_neg", "% n_kwh_pos_fact_cero", "% n_kwh_cero_fact_pos"]] = [100 * zn.loc["TOTAL", c_] / zn.loc["TOTAL", "n"] for c_ in ["n_fact_neg", "n_kwh_pos_fact_cero", "n_kwh_cero_fact_pos"]]
display(zn.rename(columns={"n": "filas", "n_fact_neg": "facturación < 0", "n_kwh_pos_fact_cero": "kWh>0 y fact=0", "n_kwh_cero_fact_pos": "kWh=0 y fact>0",
                           "% n_fact_neg": "% fact<0", "% n_kwh_pos_fact_cero": "% kWh>0 y fact=0", "% n_kwh_cero_fact_pos": "% kWh=0 y fact>0"})
        .style.format("{:,.2f}", subset=["% fact<0", "% kWh>0 y fact=0", "% kWh=0 y fact>0"]).format("{:,.0f}", subset=["filas", "facturación < 0", "kWh>0 y fact=0", "kWh=0 y fact>0"]))

caso_pf0 = cachear("kwh_pos_fact_cero_prov", """SELECT provincia, COUNT(*)::BIGINT AS filas, SUM(consumo_kwh) AS kwh, MEDIAN(consumo_kwh) AS kwh_mediana
FROM clientes WHERE consumo_kwh > 0 AND facturacion_soles = 0 GROUP BY 1 ORDER BY filas DESC""")
print("Casos de kWh > 0 con facturación = 0, por provincia:")
display(caso_pf0.head(8).style.format({"filas": "{:,.0f}", "kwh": "{:,.0f}", "kwh_mediana": "{:,.1f}"}))
per_pf0 = cachear("kwh_pos_fact_cero_periodo", """SELECT periodo, COUNT(*)::BIGINT AS filas FROM clientes WHERE consumo_kwh > 0 AND facturacion_soles = 0 GROUP BY 1 ORDER BY 1""")
fig = px.bar(per_pf0.assign(mes=pd.to_datetime(per_pf0["periodo"].astype(str) + "01", format="%Y%m%d")), x="mes", y="filas",
             title="Suministros con kWh > 0 y facturación = 0, por mes (detalle 2023–2025)", labels={"mes": "Mes", "filas": "Número de suministros"}, color_discrete_sequence=[COLOR_FACTURA])
fig.update_layout(height=380); fig.show()

,filas,facturación < 0,kWh>0 y fact=0,kWh=0 y fact>0,% fact<0,% kWh>0 y fact=0,% kWh=0 y fact>0
tarifa,,,,,,,
BT5B,"11,318,396","18,445","104,888","1,872,086",0.16,0.93,16.54
MT4,"20,497",2,149,"2,763",0.01,0.73,13.48
MT2,"9,929",5,0,"9,865",0.05,0.00,99.36
MT3,"6,347",1,0,"6,303",0.02,0.00,99.31
BT5D,"65,325",314,"4,673",527,0.48,7.15,0.81
BT4,"1,397",0,0,91,0.00,0.00,6.51
BT6,"9,775",0,28,384,0.00,0.29,3.93
BT3,514,0,0,511,0.00,0.00,99.42
BT5A,459,0,0,458,0.00,0.00,99.78


Casos de kWh > 0 con facturación = 0, por provincia:


,provincia,filas,kwh,kwh_mediana
0,AZANGARO,"18,018","308,872",3.0
1,PUNO,"15,553","637,964",4.0
2,SAN ROMAN,"12,213","220,787",3.0
3,EL COLLAO,"12,029","353,056",3.0
4,HUANCANE,"10,258","270,771",4.0
5,MELGAR,"9,329","156,843",3.0
6,CHUCUITO,"8,004","355,147",3.0
7,SAN ANTONIO DE PUTINA,"5,138","106,432",4.0


## B3. Histogramas y densidades

**Qué gráficos:** (1) histograma de consumo **positivo** en escala logarítmica por tarifa; (2) lo mismo para facturación positiva; (3) zoom lineal 0–300 kWh en BT5B; (4) densidades suavizadas (KDE) del log10 del consumo por tarifa.
**Cómo leerlos:** barras normalizadas por tarifa (área = 1) para comparar *formas* aunque las tarifas tengan tamaños muy distintos. En escala log, una campana simétrica sugiere distribución aproximadamente lognormal.
**Limitación:** los ceros y valores ≤ 0 no pueden estar en una escala logarítmica; se analizan aparte (B2). El kWh se registra en valores casi enteros, lo que produce "picos" en consumos bajos.

In [11]:
def hist_log(col, where, nombre):
    h = cachear(f"hist_{nombre}", f"""SELECT tarifa, FLOOR(LOG10({col}) * 20)::INTEGER AS b, COUNT(*)::BIGINT AS n
                                     FROM clientes WHERE {where} GROUP BY 1, 2""")
    h["centro"] = 10 ** ((h["b"] + 0.5) / 20)
    h["densidad"] = h["n"] / h.groupby("tarifa")["n"].transform("sum") / 0.05      # densidad respecto a log10(x)
    return h

h_k = hist_log("consumo_kwh", f"consumo_kwh > 0 AND tarifa IN {sql_lista(TARIFAS_CON_KWH)}", "consumo_log")
h_f = hist_log("facturacion_soles", "facturacion_soles > 0", "fact_log")

for h, titulo, xt in [(h_k, "Distribución del consumo positivo por tarifa (kWh, escala log)", "Consumo (kWh, escala log)"),
                      (h_f, "Distribución de la facturación positiva por tarifa (S/, escala log)", "Facturación (S/, escala log)")]:
    fig = go.Figure()
    for tf in TARIFAS_ORDEN:
        s = h[h["tarifa"] == tf].sort_values("centro")
        if s["n"].sum() < 300: continue
        fig.add_trace(go.Bar(x=s["centro"], y=s["densidad"], name=tf, marker_color=PALETA_TAR[tf], opacity=0.6,
                             customdata=s["n"], hovertemplate=f"<b>{tf}</b><br>≈%{{x:,.1f}}<br>Densidad: %{{y:.3f}}<br>Observaciones en el intervalo: %{{customdata:,.0f}}<extra></extra>"))
    fig.update_xaxes(type="log", title_text=xt); fig.update_yaxes(title_text="Densidad (sobre log10)")
    fig.update_layout(barmode="overlay", title=titulo, height=450, legend_title="Tarifa"); fig.show()

zoom = cachear("hist_zoom_bt5b", "SELECT (FLOOR(consumo_kwh / 5) * 5)::INTEGER AS b, COUNT(*)::BIGINT AS n FROM clientes WHERE tarifa = 'BT5B' AND consumo_kwh >= 0 AND consumo_kwh < 300 GROUP BY 1 ORDER BY 1")
fig = px.bar(zoom, x="b", y="n", labels={"b": "Consumo (kWh, intervalos de 5)", "n": "Suministros-mes"}, title="BT5B: zoom 0–300 kWh (el primer intervalo incluye los ceros)",
             color_discrete_sequence=[COLOR_CONSUMO])
fig.update_layout(height=400); fig.update_yaxes(tickformat=",.0f"); fig.show()

# KDE del log10(kWh) por tarifa (sobre la muestra, solo valores positivos)
fig = go.Figure(); grid = np.linspace(-0.3, 5.0, 300)
for tf in TARIFAS_CON_KWH:
    x = muestra.loc[(muestra["tarifa"] == tf) & (muestra["consumo_kwh"] > 0), "consumo_kwh"]
    if len(x) < 2000: continue
    x = np.log10(x.sample(min(len(x), 15000), random_state=SEMILLA))
    fig.add_trace(go.Scatter(x=10 ** grid, y=stats.gaussian_kde(x)(grid), mode="lines", name=f"{tf} (n={len(x):,})", line=dict(color=PALETA_TAR[tf], width=2),
                             hovertemplate=f"<b>{tf}</b><br>%{{x:,.1f}} kWh<br>densidad %{{y:.3f}}<extra></extra>"))
fig.update_xaxes(type="log", title_text="Consumo (kWh, escala log)"); fig.update_yaxes(title_text="Densidad (KDE sobre log10 kWh)")
fig.update_layout(title="Densidad del consumo positivo por tarifa (muestra estratificada)", height=430); fig.show()

## B4. Boxplots por tarifa y por provincia

**Qué se compara:** mediana, cuartiles y dispersión del consumo y la facturación positivos entre tarifas; y del consumo BT5B entre provincias.
**Cómo leerlos:** la caja es el 50 % central; los bigotes siguen la regla de Tukey; se ocultan los puntos individuales (los atípicos se listan en B7). Eje logarítmico.
**Limitación:** usa la muestra estratificada: la comparación entre tarifas es válida para *forma y nivel*, no para tamaño.

In [12]:
fig = make_subplots(rows=1, cols=2, subplot_titles=("Consumo positivo (kWh)", "Facturación positiva (S/)"), horizontal_spacing=0.1)
for tf in TARIFAS_ORDEN:
    k = muestra.loc[(muestra["tarifa"] == tf) & (muestra["consumo_kwh"] > 0), "consumo_kwh"]
    f = muestra.loc[(muestra["tarifa"] == tf) & (muestra["facturacion_soles"] > 0), "facturacion_soles"]
    if tf in TARIFAS_CON_KWH and len(k) >= 30:
        fig.add_trace(go.Box(y=k, name=tf, marker_color=PALETA_TAR[tf], boxpoints=False, legendgroup=tf, showlegend=True), row=1, col=1)
    if len(f) >= 30:
        fig.add_trace(go.Box(y=f, name=tf, marker_color=PALETA_TAR[tf], boxpoints=False, legendgroup=tf, showlegend=False), row=1, col=2)
fig.update_yaxes(type="log", title_text="kWh (log)", row=1, col=1); fig.update_yaxes(type="log", title_text="Soles (log)", row=1, col=2)
fig.update_xaxes(title_text="Tarifa"); fig.update_layout(title="Distribución por tarifa (muestra estratificada)", height=500); fig.show()

b5 = muestra[(muestra["tarifa"] == "BT5B") & (muestra["consumo_kwh"] > 0) & (muestra["provincia"] != "LIMA")]
orden = b5.groupby("provincia")["consumo_kwh"].median().sort_values().index
fig = go.Figure()
for pv in orden:
    s = b5.loc[b5["provincia"] == pv, "consumo_kwh"]
    fig.add_trace(go.Box(y=s, name=pv, boxpoints=False, showlegend=False, hovertemplate=f"<b>{pv}</b><br>n={len(s):,}<extra></extra>"))
fig.update_yaxes(type="log", title_text="Consumo BT5B (kWh, log)"); fig.update_xaxes(title_text="Provincia", tickangle=-35)
fig.update_layout(title="BT5B: consumo positivo por provincia (ordenado por mediana)", height=480); fig.show()

grupos = [g["consumo_kwh"].values for _, g in b5.groupby("provincia") if len(g) >= 30]
if len(grupos) >= 2:
    Hk, pk = stats.kruskal(*grupos); nk = sum(len(g) for g in grupos)
    eps2 = (Hk - len(grupos) + 1) / (nk - len(grupos))
    print(f"Kruskal–Wallis (consumo BT5B>0 entre {len(grupos)} provincias): H = {Hk:,.1f}, p = {pk:.2e}, tamaño de efecto ε² = {eps2:.3f}")
    print("Con muestras grandes casi cualquier diferencia es 'significativa'; use ε² (≈0.01 pequeño, 0.06 mediano, 0.14 grande) para juzgar la relevancia práctica.")

Kruskal–Wallis (consumo BT5B>0 entre 13 provincias): H = 4,738.6, p = 0.00e+00, tamaño de efecto ε² = 0.142
Con muestras grandes casi cualquier diferencia es 'significativa'; use ε² (≈0.01 pequeño, 0.06 mediano, 0.14 grande) para juzgar la relevancia práctica.


## B5. ¿Qué distribución teórica describe el consumo y la facturación? (ajuste y Q‑Q)

**Método.** Sobre **valores positivos de BT5B** (el 99 % de las filas; subconjunto declarado) ajustamos por máxima verosimilitud: **normal**, **lognormal**, **gamma** y **Weibull** (con ubicación fijada en 0 para las tres últimas). Comparamos **AIC/BIC** (menor = mejor ajuste penalizado) y la distancia **KS** (D).
**Gráficos Q‑Q:** cuantiles de los datos vs. cuantiles teóricos. Si los puntos siguen la diagonal, el ajuste es bueno; las desviaciones en las colas indican qué extremos no captura el modelo.
**Supuestos y limitaciones (importantes):**
* Con decenas de miles de datos, **cualquier modelo se rechaza** en una prueba de hipótesis; por eso no se usan p‑valores como criterio y se reporta la distancia KS y el AIC/BIC.
* El kWh viene en valores casi enteros (discreto) y hay mezcla de clientes: un único modelo teórico rara vez describe todo.
* El ajuste es sobre una **submuestra de 20 000** filas con semilla fija. No se fuerza ninguna distribución.

In [13]:
CANDIDATAS = {"Normal": stats.norm, "Lognormal": stats.lognorm, "Gamma": stats.gamma, "Weibull": stats.weibull_min}
def ajustar(x):
    n = len(x); filas = []; params = {}
    for nombre, d in CANDIDATAS.items():
        p = d.fit(x) if nombre == "Normal" else d.fit(x, floc=0)
        k = 2 if nombre == "Normal" else 2                      # normal: μ,σ | resto: forma+escala (ubicación fija)
        ll = np.sum(d.logpdf(x, *p))
        filas.append({"distribución": nombre, "log-verosimilitud": ll, "AIC": 2 * k - 2 * ll, "BIC": k * np.log(n) - 2 * ll,
                      "KS (D)": stats.kstest(x, d.cdf, args=p).statistic})
        params[nombre] = p
    return pd.DataFrame(filas).set_index("distribución").sort_values("AIC"), params

def qq_fig(x, params, nombres, titulo, ejes):
    m_ = 300; pr = (np.arange(1, m_ + 1) - 0.5) / m_; emp = np.quantile(x, pr)
    fig = make_subplots(rows=1, cols=len(nombres), subplot_titles=nombres, horizontal_spacing=0.07)
    for j, nm in enumerate(nombres, start=1):
        th = CANDIDATAS[nm].ppf(pr, *params[nm]); ok = np.isfinite(th) & (th > 0) & (emp > 0)
        fig.add_trace(go.Scatter(x=th[ok], y=emp[ok], mode="markers", marker=dict(size=5, color=COLOR_DETALLE), showlegend=False,
                                 hovertemplate="Teórico: %{x:,.2f}<br>Observado: %{y:,.2f}<extra></extra>"), row=1, col=j)
        lo, hi = emp[ok].min(), emp[ok].max()
        fig.add_trace(go.Scatter(x=[lo, hi], y=[lo, hi], mode="lines", line=dict(color="gray", dash="dash"), showlegend=False, hoverinfo="skip"), row=1, col=j)
        fig.update_xaxes(type="log", title_text=f"Cuantil teórico ({ejes})", row=1, col=j); fig.update_yaxes(type="log", row=1, col=j)
    fig.update_yaxes(title_text=f"Cuantil observado ({ejes})", row=1, col=1)
    fig.update_layout(title=titulo, height=430); return fig

AJUSTES = {}
for var, col, etq in [("Consumo BT5B > 0", "consumo_kwh", "kWh"), ("Facturación BT5B > 0", "facturacion_soles", "S/")]:
    x = muestra.loc[(muestra["tarifa"] == "BT5B") & (muestra[col] > 0), col]
    x = x.sample(min(len(x), 20000), random_state=SEMILLA).values
    tabla, params = ajustar(x)
    AJUSTES[var] = (tabla, x)
    print(f"\n=== {var}: n = {len(x):,} | proporción de valores enteros: {np.mean(x == np.round(x)):.1%} ===")
    display(tabla.style.format({"log-verosimilitud": "{:,.0f}", "AIC": "{:,.0f}", "BIC": "{:,.0f}", "KS (D)": "{:.3f}"}))
    mejor = tabla.index[0]
    print(f"Menor AIC: {mejor} (ΔAIC respecto al segundo: {tabla['AIC'].iloc[1] - tabla['AIC'].iloc[0]:,.0f}).")
    qq_fig(x, params, ["Normal", "Lognormal", "Gamma"], f"Gráficos Q‑Q — {var} (ejes log)", etq).show()


=== Consumo BT5B > 0: n = 20,000 | proporción de valores enteros: 100.0% ===


,log-verosimilitud,AIC,BIC,KS (D)
distribución,,,,
Lognormal,"-96,073","192,151","192,167",0.044
Weibull,"-97,378","194,761","194,777",0.076
Gamma,"-98,816","197,636","197,652",0.089
Normal,"-132,703","265,411","265,427",0.377


Menor AIC: Lognormal (ΔAIC respecto al segundo: 2,610).



=== Facturación BT5B > 0: n = 20,000 | proporción de valores enteros: 9.2% ===


,log-verosimilitud,AIC,BIC,KS (D)
distribución,,,,
Lognormal,"-93,428","186,861","186,876",0.114
Weibull,"-97,427","194,859","194,875",0.193
Gamma,"-99,266","198,535","198,551",0.173
Normal,"-134,623","269,251","269,266",0.390


Menor AIC: Lognormal (ΔAIC respecto al segundo: 7,998).


## B6. Relación consumo–facturación y casos con razón S/kWh fuera de lo habitual

**Qué se hace:** sobre la muestra con valores positivos, se ajusta la recta log‑log y se marcan en rojo los suministros‑mes cuya razón S/kWh se aleja más de **3.5 desviaciones robustas (MAD)** de la mediana de su tarifa.
**Cómo leerlo:** son puntos *distintos al patrón de su tarifa*; pueden deberse a cargos fijos con consumo mínimo, ajustes, refacturaciones, etc. No se califican como error ni irregularidad.

In [14]:
pos = pos.copy()
pos["lr"] = np.log(pos["facturacion_soles"] / pos["consumo_kwh"])
g = pos.groupby("tarifa")["lr"]
pos["z_razon"] = (pos["lr"] - g.transform("median")) / (1.4826 * g.transform(lambda s: (s - s.median()).abs().median()).replace(0, np.nan))
pos["atipico_razon"] = pos["z_razon"].abs() > 3.5
print(f"Suministros-mes de la muestra con razón S/kWh atípica dentro de su tarifa: {pos['atipico_razon'].sum():,} de {len(pos):,} ({100*pos['atipico_razon'].mean():.2f}%)")
print("Por tarifa (% de la muestra de esa tarifa):")
display((pos.groupby("tarifa")["atipico_razon"].mean() * 100).to_frame("% atípicos").T.style.format("{:.2f}"))

sl = stats.linregress(np.log(pos["consumo_kwh"]), np.log(pos["facturacion_soles"]))
vis = pos.sample(min(60000, len(pos)), random_state=SEMILLA)
fig = go.Figure()
for flag, color, nm in [(False, "lightgray", "Razón dentro de lo habitual"), (True, "crimson", "Razón atípica en su tarifa")]:
    s = vis[vis["atipico_razon"] == flag]
    fig.add_trace(go.Scattergl(x=s["consumo_kwh"], y=s["facturacion_soles"], mode="markers", name=nm, marker=dict(size=4, color=color, opacity=0.5),
                               customdata=np.stack([s["tarifa"], s["provincia"], s["periodo"], s["facturacion_soles"] / s["consumo_kwh"]], axis=1),
                               hovertemplate="Tarifa %{customdata[0]} · %{customdata[1]} · %{customdata[2]}<br>%{x:,.1f} kWh → S/ %{y:,.1f}<br>S/kWh: %{customdata[3]:.2f}<extra></extra>"))
xs = np.array([pos["consumo_kwh"].min(), pos["consumo_kwh"].max()])
fig.add_trace(go.Scatter(x=xs, y=np.exp(sl.intercept) * xs ** sl.slope, mode="lines", name=f"Ajuste log‑log (pendiente {sl.slope:.2f})", line=dict(color="black")))
fig.update_xaxes(type="log", title_text="Consumo (kWh, log)"); fig.update_yaxes(type="log", title_text="Facturación (S/, log)")
fig.update_layout(title="Consumo vs. facturación con razón S/kWh atípica resaltada (muestra)", height=560, legend=dict(orientation="h", y=-0.2)); fig.show()

Suministros-mes de la muestra con razón S/kWh atípica dentro de su tarifa: 8,566 de 97,405 (8.79%)
Por tarifa (% de la muestra de esa tarifa):


tarifa,BT4,BT5B,BT5D,BT6,MT4
% atípicos,5.06,12.95,5.30,16.12,4.56


## B7. Valores atípicos de consumo (IQR y métodos robustos) y tabla de casos

**Métodos** (sobre consumos **positivos** de cada tarifa con kWh informado, calculados en DuckDB sobre todas las filas):
1. **IQR clásico** en kWh: > Q3 + 1.5·IQR.
2. **IQR sobre el logaritmo** (más apropiado para datos con cola derecha): > exp(Q3ₗₙ + 1.5·IQRₗₙ); y límite "extremo" con 3·IQR.
3. **Puntaje robusto** z = (ln x − mediana) / (1.4826·MAD) para ordenar los casos.
**Importante:** "atípico" significa *lejos de lo habitual de su tarifa*, no "error" ni "fraude". En media tensión, consumos grandes son normales para su tipo de cliente.

In [15]:
fen = cachear("limites_atipicos", f"""
WITH base AS (SELECT tarifa, consumo_kwh AS x, LN(consumo_kwh) AS lx FROM clientes WHERE consumo_kwh > 0 AND tarifa IN {sql_lista(TARIFAS_CON_KWH)}),
m AS (SELECT tarifa, median(lx) AS med_ln FROM base GROUP BY 1)
SELECT b.tarifa, COUNT(*)::BIGINT AS n_pos, quantile_cont(b.x, 0.25) AS q1, quantile_cont(b.x, 0.75) AS q3,
       quantile_cont(b.lx, 0.25) AS q1_ln, quantile_cont(b.lx, 0.75) AS q3_ln, MAX(m.med_ln) AS med_ln, median(ABS(b.lx - m.med_ln)) AS mad_ln
FROM base b JOIN m USING (tarifa) GROUP BY 1
""")
fen["iqr"] = fen["q3"] - fen["q1"]; fen["iqr_ln"] = fen["q3_ln"] - fen["q1_ln"]
fen["raw_hi"] = fen["q3"] + 1.5 * fen["iqr"]
fen["ln_hi"] = np.exp(fen["q3_ln"] + 1.5 * fen["iqr_ln"]); fen["ln_ext"] = np.exp(fen["q3_ln"] + 3 * fen["iqr_ln"]); fen["ln_lo"] = np.exp(fen["q1_ln"] - 1.5 * fen["iqr_ln"])
con.register("fen", fen)

cont = cachear("conteo_atipicos", """
SELECT c.tarifa,
  SUM(CASE WHEN c.consumo_kwh > f.raw_hi THEN 1 ELSE 0 END)::BIGINT AS n_iqr_raw,
  SUM(CASE WHEN c.consumo_kwh > f.ln_hi THEN 1 ELSE 0 END)::BIGINT AS n_iqr_log,
  SUM(CASE WHEN c.consumo_kwh > f.ln_ext THEN 1 ELSE 0 END)::BIGINT AS n_iqr_log_extremo,
  SUM(CASE WHEN c.consumo_kwh < f.ln_lo THEN 1 ELSE 0 END)::BIGINT AS n_bajo_log
FROM clientes c JOIN fen f USING (tarifa) WHERE c.consumo_kwh > 0 GROUP BY 1
""").set_index("tarifa").join(fen.set_index("tarifa")[["n_pos", "raw_hi", "ln_hi", "ln_ext"]])
for c_ in ["n_iqr_raw", "n_iqr_log", "n_iqr_log_extremo", "n_bajo_log"]:
    cont["% " + c_] = 100 * cont[c_] / cont["n_pos"]
display(cont.loc[[x for x in TARIFAS_CON_KWH if x in cont.index]][["n_pos", "raw_hi", "n_iqr_raw", "% n_iqr_raw", "ln_hi", "n_iqr_log", "% n_iqr_log", "ln_ext", "n_iqr_log_extremo", "% n_iqr_log_extremo", "n_bajo_log"]]
        .rename(columns={"n_pos": "obs. positivas", "raw_hi": "límite IQR (kWh)", "n_iqr_raw": "sobre IQR", "% n_iqr_raw": "% sobre IQR", "ln_hi": "límite IQR-log (kWh)",
                         "n_iqr_log": "sobre IQR-log", "% n_iqr_log": "% sobre IQR-log", "ln_ext": "límite extremo-log (kWh)", "n_iqr_log_extremo": "sobre extremo-log",
                         "% n_iqr_log_extremo": "% sobre extremo-log", "n_bajo_log": "bajo límite inferior-log"})
        .style.format("{:,.1f}", precision=1).format("{:,.0f}", subset=["obs. positivas", "sobre IQR", "sobre IQR-log", "sobre extremo-log", "bajo límite inferior-log"]))
print("Lectura: el IQR sobre datos asimétricos marca muchos más casos (la cola larga es normal); el IQR-log es más selectivo.")

top_at = cachear("top_atipicos", """
SELECT c.periodo, c.provincia, c.distrito, c.tarifa, c.fecha_alta, c.consumo_kwh, c.facturacion_soles,
       c.facturacion_soles / c.consumo_kwh AS soles_por_kwh, EXP(f.med_ln) AS mediana_tarifa_kwh,
       c.consumo_kwh / EXP(f.med_ln) AS veces_mediana_tarifa, (LN(c.consumo_kwh) - f.med_ln) / (1.4826 * NULLIF(f.mad_ln, 0)) AS z_robusto
FROM clientes c JOIN fen f USING (tarifa) WHERE c.consumo_kwh > 0 ORDER BY z_robusto DESC LIMIT 30
""")
top_at["fecha_alta"] = top_at["fecha_alta"].where(top_at["fecha_alta"] > pd.Timestamp(FECHA_ALTA_DUDOSA_HASTA))      # alta dudosa → vacío
print("Los 30 consumos más atípicos (por puntaje robusto dentro de su tarifa). 'fecha_alta' vacía = fecha dudosa/por defecto. SIN calificar como error ni fraude.")
print("Varias filas pueden corresponder al mismo suministro en meses distintos (misma ubicación y fecha de alta), pero sin identificador persistente no se puede confirmar.")
display(top_at.style.format({"consumo_kwh": "{:,.1f}", "facturacion_soles": "{:,.1f}", "soles_por_kwh": "{:.2f}", "mediana_tarifa_kwh": "{:,.1f}", "veces_mediana_tarifa": "{:,.0f}", "z_robusto": "{:.1f}"}))
con.unregister("fen")

neg = cachear("top_fact_negativa", """SELECT periodo, provincia, distrito, tarifa, fecha_alta, consumo_kwh, facturacion_soles FROM clientes WHERE facturacion_soles < 0 ORDER BY facturacion_soles ASC LIMIT 10""")
print("\nLas 10 facturaciones negativas de mayor magnitud (posibles ajustes/regularizaciones; solo se describen):")
display(neg.style.format({"consumo_kwh": "{:,.1f}", "facturacion_soles": "{:,.1f}"}))

FloatProgress(value=0.0, layout=Layout(width='auto'), style=ProgressStyle(bar_color='black'))

,obs. positivas,límite IQR (kWh),sobre IQR,% sobre IQR,límite IQR-log (kWh),sobre IQR-log,% sobre IQR-log,límite extremo-log (kWh),sobre extremo-log,% sobre extremo-log,bajo límite inferior-log
tarifa,,,,,,,,,,,
BT5B,"9,378,801",134.5,"709,604",7.6,"1,383.3","29,990",0.3,"32,992.7",1,0.0,19
MT4,"17,636","7,302.6","2,132",12.1,"57,463.4",260,1.5,"1,031,496.7",0,0.0,258
BT5D,"64,677","1,452.5","6,432",9.9,"7,886.7",714,1.1,"94,816.8",0,0.0,722
BT4,"1,304","9,427.6",140,10.7,"40,735.2",0,0.0,"380,499.0",0,0.0,53
BT6,"9,391",759.7,785,8.4,"3,019.3",132,1.4,"25,680.0",0,0.0,416


Lectura: el IQR sobre datos asimétricos marca muchos más casos (la cola larga es normal); el IQR-log es más selectivo.
Los 30 consumos más atípicos (por puntaje robusto dentro de su tarifa). 'fecha_alta' vacía = fecha dudosa/por defecto. SIN calificar como error ni fraude.
Varias filas pueden corresponder al mismo suministro en meses distintos (misma ubicación y fecha de alta), pero sin identificador persistente no se puede confirmar.


,periodo,provincia,distrito,tarifa,fecha_alta,consumo_kwh,facturacion_soles,soles_por_kwh,mediana_tarifa_kwh,veces_mediana_tarifa,z_robusto
0,202311,PUNO,ATUNCOLLA,BT5B,2022-04-29 00:00:00,"52,353.0","50,528.4",0.97,23.0,"2,276",5.1
1,202504,SAN ANTONIO DE PUTINA,ANANEA,BT5B,2016-09-20 00:00:00,"26,615.0","27,340.4",1.03,23.0,"1,157",4.6
2,202302,SAN ANTONIO DE PUTINA,ANANEA,BT5B,2018-09-03 00:00:00,"21,345.0","26,156.3",1.23,23.0,928,4.5
3,202309,SAN ANTONIO DE PUTINA,ANANEA,BT5B,2020-02-05 00:00:00,"19,656.0","21,296.3",1.08,23.0,855,4.4
4,202301,PUNO,PUNO,BT5B,2015-07-21 00:00:00,"17,603.0","21,257.6",1.21,23.0,765,4.4
5,202309,PUNO,PUNO,BT5B,2015-07-21 00:00:00,"17,434.0","18,734.8",1.07,23.0,758,4.4
6,202401,PUNO,PUNO,BT5B,2015-07-21 00:00:00,"17,432.0","20,362.3",1.17,23.0,758,4.4
7,202302,PUNO,PUNO,BT5B,2015-07-21 00:00:00,"17,299.0","20,013.9",1.16,23.0,752,4.4
8,202311,PUNO,PUNO,BT5B,2015-07-21 00:00:00,"17,297.0","19,578.3",1.13,23.0,752,4.4
9,202402,PUNO,PUNO,BT5B,2015-07-21 00:00:00,"17,292.0","20,065.4",1.16,23.0,752,4.4



Las 10 facturaciones negativas de mayor magnitud (posibles ajustes/regularizaciones; solo se describen):


,periodo,provincia,distrito,tarifa,fecha_alta,consumo_kwh,facturacion_soles
0,202407,SAN ANTONIO DE PUTINA,ANANEA,MT2,2022-08-16 00:00:00,0.0,"-60,645.4"
1,202503,SAN ANTONIO DE PUTINA,ANANEA,MT4,2023-11-23 00:00:00,0.0,"-14,915.2"
2,202401,SAN ANTONIO DE PUTINA,ANANEA,BT5B,2019-04-08 00:00:00,543.0,"-11,296.8"
3,202307,AZANGARO,AZANGARO,MT2,1997-01-09 00:00:00,0.0,"-11,150.5"
4,202306,AZANGARO,AZANGARO,MT2,1997-01-09 00:00:00,0.0,"-9,603.8"
5,202307,HUANCANE,TARACO,MT2,2000-01-10 00:00:00,0.0,"-9,014.8"
6,202306,HUANCANE,TARACO,MT2,2000-01-10 00:00:00,0.0,"-8,763.9"
7,202405,SAN ROMAN,JULIACA,BT5B,1991-01-03 00:00:00,0.0,"-7,530.5"
8,202505,SAN ANTONIO DE PUTINA,ANANEA,BT5B,2021-07-06 00:00:00,0.0,"-5,690.4"
9,202302,SAN ANTONIO DE PUTINA,ANANEA,BT5B,2022-05-01 00:00:00,527.0,"-3,687.5"


# PARTE C · Perfiles de consumo mediante clustering

**Pregunta:** ¿podemos agrupar suministros (o unidades comparables) según su patrón de consumo?

## C1. ¿Existe un identificador persistente de suministro?

Para describir el *patrón de un suministro* a lo largo del tiempo necesitamos poder seguir al **mismo** suministro mes a mes. Se prueba con `codigo_cliente`:
* ¿Es un correlativo que se reinicia cada mes (1…N)?
* Si un mismo código aparece en varios meses, ¿conserva su fecha de alta, su ubicación y su tarifa? (un suministro real debería conservarlas).

In [16]:
corr_cod = q("""SELECT periodo, COUNT(*)::BIGINT AS filas, MIN(codigo_cliente) AS min_codigo, MAX(codigo_cliente) AS max_codigo,
                       COUNT(DISTINCT codigo_cliente)::BIGINT AS codigos_distintos FROM clientes GROUP BY 1 ORDER BY 1""")
es_correlativo = ((corr_cod["min_codigo"] == 1) & (corr_cod["max_codigo"] == corr_cod["filas"]) & (corr_cod["codigos_distintos"] == corr_cod["filas"])).mean()
print(f"Meses en que el código va exactamente de 1 a N (N = filas del mes, sin repetirse): {100*es_correlativo:.0f}% de {len(corr_cod)} meses")

estab = cachear("estabilidad_codigo", """
SELECT COUNT(*)::BIGINT AS codigos,
       SUM(CASE WHEN n_per > 1 THEN 1 ELSE 0 END)::BIGINT AS en_varios_meses,
       SUM(CASE WHEN n_per > 1 AND n_alta > 1 THEN 1 ELSE 0 END)::BIGINT AS cambia_fecha_alta,
       SUM(CASE WHEN n_per > 1 AND n_loc > 1 THEN 1 ELSE 0 END)::BIGINT AS cambia_distrito,
       SUM(CASE WHEN n_per > 1 AND n_tar > 1 THEN 1 ELSE 0 END)::BIGINT AS cambia_tarifa,
       SUM(CASE WHEN n_per > 1 AND n_alta = 1 AND n_loc = 1 AND n_tar = 1 THEN 1 ELSE 0 END)::BIGINT AS totalmente_estable
FROM (SELECT codigo_cliente, COUNT(*) AS n_per, COUNT(DISTINCT fecha_alta) AS n_alta,
             COUNT(DISTINCT provincia || '|' || distrito) AS n_loc, COUNT(DISTINCT tarifa) AS n_tar
      FROM clientes GROUP BY 1)
""").iloc[0]
base = estab["en_varios_meses"]
print(f"Códigos distintos: {estab['codigos']:,} | presentes en más de un mes: {base:,}")
for k_, etq in [("cambia_fecha_alta", "cambian de fecha de alta"), ("cambia_distrito", "cambian de distrito"), ("cambia_tarifa", "cambian de tarifa"), ("totalmente_estable", "son totalmente estables (alta, distrito y tarifa)")]:
    print(f"  · {etq}: {estab[k_]:,} ({100*estab[k_]/base:.1f}% de los que aparecen en varios meses)")
ID_PERSISTENTE = (100 * estab["cambia_fecha_alta"] / base) < 5
print("\nCONCLUSIÓN:", "el código parece un identificador estable." if ID_PERSISTENTE else
      "`codigo_cliente` NO es un identificador persistente de suministro (es un correlativo mensual): no se construyen perfiles longitudinales por suministro.")

Meses en que el código va exactamente de 1 a N (N = filas del mes, sin repetirse): 100% de 33 meses


FloatProgress(value=0.0, layout=Layout(width='auto'), style=ProgressStyle(bar_color='black'))

Códigos distintos: 355,637 | presentes en más de un mes: 355,536
  · cambian de fecha de alta: 355,265 (99.9% de los que aparecen en varios meses)
  · cambian de distrito: 262,706 (73.9% de los que aparecen en varios meses)
  · cambian de tarifa: 82,241 (23.1% de los que aparecen en varios meses)
  · son totalmente estables (alta, distrito y tarifa): 271 (0.1% de los que aparecen en varios meses)

CONCLUSIÓN: `codigo_cliente` NO es un identificador persistente de suministro (es un correlativo mensual): no se construyen perfiles longitudinales por suministro.


**Alternativas metodológicamente válidas.** Como no podemos seguir suministros individuales, hacemos dos agrupaciones con unidades que **sí** son comparables:

* **C2 — Perfiles de suministro‑mes:** cada *observación* (un suministro en un mes) se agrupa según su nivel de consumo y facturación. Describe **tipos de comportamiento mensual**, no suministros seguidos en el tiempo.
* **C3 — Perfiles de distrito:** cada **distrito** (unidad persistente, 33 meses de observación) se describe con consumo medio, variabilidad, proporción de ceros, razón S/kWh, mezcla tarifaria, estacionalidad y crecimiento, y se agrupa.

## C2. Perfiles de suministro‑mes (K‑means)

**Datos:** muestra **proporcional y reproducible** (semilla fija) de ~150 000 suministros‑mes de tarifas con kWh informado, 2023–2025. No se agrupan los 11.4 millones de filas: con dos variables bastan 150 000 para estimar la estructura, y se comprueba la estabilidad.
**Variables (justificación):**
* `log(1 + kWh)`: el consumo es muy asimétrico y tiene ceros; el logaritmo con +1 lo hace manejable sin descartar los ceros.
* `log(1 + S/)` con facturación negativa llevada a 0 (18 mil filas): resume el nivel económico y captura el efecto de cargos fijos.
* **Valores extremos:** se limitan al percentil 99.9 de cada variable para que unos pocos casos no creen grupos de un solo elemento (no se eliminan del análisis posterior de caracterización).
* Se **estandarizan** (media 0, desviación 1) para que ninguna variable domine.
**Selección de K:** método del codo (inercia), **silueta** (−1 a 1; >0.5 estructura razonable, 0.25–0.5 débil, <0.25 prácticamente inexistente) y Davies–Bouldin (menor es mejor). Se evalúa k de 2 a 8, pero se **elige entre 3 y 8** porque k = 2 suele separar solo ceros de positivos (se verifica con un diagnóstico).

In [17]:
N_CLUSTER = 150000
n_elig = con.execute(f"SELECT COUNT(*) FROM clientes WHERE tarifa IN {sql_lista(TARIFAS_CON_KWH)}").fetchone()[0]
tasa_c = min(1.0, N_CLUSTER / n_elig)
mc = cachear("muestra_cluster", f"""
SELECT periodo, provincia, tarifa, fecha_alta, consumo_kwh, facturacion_soles FROM clientes
WHERE tarifa IN {sql_lista(TARIFAS_CON_KWH)} AND {sql_hash_u(SEMILLA + 1)} < {int(tasa_c * 1000000)}
""")
print(f"Elegibles (tarifas con kWh, 2023–2025): {n_elig:,} | muestra para clustering: {len(mc):,} ({100*tasa_c:.2f}%) | semilla {SEMILLA + 1}")

mc["fact_pos"] = mc["facturacion_soles"].clip(lower=0)
X = np.column_stack([np.log1p(mc["consumo_kwh"]), np.log1p(mc["fact_pos"])])
lim = np.percentile(X, 99.9, axis=0)
print(f"Observaciones recortadas al P99.9: {(X > lim).any(axis=1).sum():,}")
X = np.minimum(X, lim)
Xs = StandardScaler().fit_transform(X)

def evaluar_k(Xs, ks, sil_n=10000):
    rng = np.random.RandomState(SEMILLA)
    idx = rng.choice(len(Xs), min(sil_n, len(Xs)), replace=False)
    filas = []
    for k in ks:
        km = KMeans(n_clusters=k, n_init=10, random_state=SEMILLA).fit(Xs)
        lab = km.labels_
        filas.append({"k": k, "inercia": km.inertia_, "silueta": silhouette_score(Xs[idx], lab[idx]), "Davies-Bouldin": davies_bouldin_score(Xs, lab),
                      "Calinski-Harabasz": calinski_harabasz_score(Xs, lab), "tamaño del grupo menor (%)": 100 * np.bincount(lab).min() / len(lab)})
    return pd.DataFrame(filas).set_index("k")

def graf_metricas(ev, titulo, desde=2):
    fig = make_subplots(rows=1, cols=3, subplot_titles=("Método del codo: inercia", "Silueta (mayor = mejor)", "Davies–Bouldin (menor = mejor)"), horizontal_spacing=0.08)
    for j, (col, color) in enumerate([("inercia", COLOR_DETALLE), ("silueta", COLOR_CONSUMO), ("Davies-Bouldin", COLOR_FACTURA)], start=1):
        fig.add_trace(go.Scatter(x=ev.index, y=ev[col], mode="lines+markers", line=dict(color=color), showlegend=False,
                                 hovertemplate="k = %{x}<br>" + col + " = %{y:.3f}<extra></extra>"), row=1, col=j)
    kb = ev.loc[desde:, "silueta"].idxmax()
    fig.add_vline(x=kb, line_dash="dot", line_color="gray", row=1, col=2)
    fig.update_xaxes(title_text="Número de grupos (k)", dtick=1); fig.update_layout(title=titulo, height=380); return fig

EV1 = evaluar_k(Xs, range(2, 9))
display(EV1.style.format({"inercia": "{:,.0f}", "silueta": "{:.3f}", "Davies-Bouldin": "{:.3f}", "Calinski-Harabasz": "{:,.0f}", "tamaño del grupo menor (%)": "{:.1f}"}))
graf_metricas(EV1, "Selección del número de perfiles de suministro‑mes", desde=3).show()

# Diagnóstico de k = 2: ¿solo separa los ceros de los positivos?
lab2 = KMeans(n_clusters=2, n_init=10, random_state=SEMILLA).fit_predict(Xs)
cero = (mc["consumo_kwh"].values == 0)
g_bajo = lab2 == pd.Series(mc["consumo_kwh"].values).groupby(lab2).median().idxmin()
print(f"Diagnóstico k = 2: el grupo de menor consumo reúne {100*cero[g_bajo].sum()/max(cero.sum(),1):.1f}% de los suministros-mes con kWh = 0 y "
      f"{100*(~cero[g_bajo]).sum()/max((~cero).sum(),1):.1f}% de los que tienen kWh > 0 → "
      "una división en 2 grupos solo distingue 'poco/nada de consumo' de 'consumo', por eso se elige k entre 3 y 8.")
K1 = int(EV1.loc[3:, "silueta"].idxmax())
print(f"Criterio: k ∈ [3, 8] con mayor silueta = {K1} (silueta {EV1.loc[K1, 'silueta']:.3f}; grupo más pequeño: {EV1.loc[K1, 'tamaño del grupo menor (%)']:.1f}% de la muestra).")

Elegibles (tarifas con kWh, 2023–2025): 11,415,390 | muestra para clustering: 149,509 (1.31%) | semilla 43
Observaciones recortadas al P99.9: 176


,inercia,silueta,Davies-Bouldin,Calinski-Harabasz,tamaño del grupo menor (%)
k,,,,,
2,"103,805",0.571,0.588,"281,165",42.4
3,"59,990",0.521,0.606,"297,857",28.8
4,"39,839",0.526,0.615,"324,215",9.5
5,"31,024",0.552,0.570,"322,874",2.2
6,"22,774",0.521,0.577,"362,703",2.1
7,"17,030",0.526,0.574,"412,600",2.1
8,"13,917",0.517,0.571,"437,536",1.5


Diagnóstico k = 2: el grupo de menor consumo reúne 100.0% de los suministros-mes con kWh = 0 y 49.1% de los que tienen kWh > 0 → una división en 2 grupos solo distingue 'poco/nada de consumo' de 'consumo', por eso se elige k entre 3 y 8.
Criterio: k ∈ [3, 8] con mayor silueta = 5 (silueta 0.552; grupo más pequeño: 2.2% de la muestra).


In [18]:
km1 = KMeans(n_clusters=K1, n_init=10, random_state=SEMILLA).fit(Xs)
mc["raw"] = km1.labels_

# Estabilidad: dos mitades independientes → ¿asignan igual al conjunto completo?
perm = np.random.RandomState(SEMILLA).permutation(len(Xs)); mid = len(Xs) // 2
a_ = KMeans(n_clusters=K1, n_init=10, random_state=1).fit(Xs[perm[:mid]]); b_ = KMeans(n_clusters=K1, n_init=10, random_state=2).fit(Xs[perm[mid:]])
ARI1 = adjusted_rand_score(a_.predict(Xs), b_.predict(Xs))
print(f"Estabilidad (índice de Rand ajustado entre dos mitades; 1 = idéntico): {ARI1:.3f}")

# Nombrar los grupos por nivel de consumo creciente
orden = mc.groupby("raw")["consumo_kwh"].agg(["median", "mean"]).sort_values(["median", "mean"]).index.tolist()
mc["perfil"] = mc["raw"].map({r: f"Perfil {i + 1}" for i, r in enumerate(orden)})
PERFILES = [f"Perfil {i + 1}" for i in range(K1)]
mc["fecha_periodo"] = pd.to_datetime(mc["periodo"].astype(str) + "01", format="%Y%m%d")
alta_ok = mc["fecha_alta"].where(mc["fecha_alta"] > pd.Timestamp(FECHA_ALTA_DUDOSA_HASTA))
mc["antiguedad_anios"] = (mc["fecha_periodo"] - alta_ok).dt.days / 365.25

def moda(s): return s.value_counts().index[0]
car = mc.groupby("perfil").agg(
    observaciones=("consumo_kwh", "size"), kwh_media=("consumo_kwh", "mean"), kwh_mediana=("consumo_kwh", "median"),
    kwh_p25=("consumo_kwh", lambda s: s.quantile(.25)), kwh_p75=("consumo_kwh", lambda s: s.quantile(.75)),
    soles_mediana=("facturacion_soles", "median"), pct_kwh_cero=("consumo_kwh", lambda s: 100 * (s == 0).mean()),
    pct_BT5B=("tarifa", lambda s: 100 * (s == "BT5B").mean()), antiguedad_mediana=("antiguedad_anios", "median"),
    provincia_principal=("provincia", moda)).reindex(PERFILES)
car["% de la muestra"] = 100 * car["observaciones"] / car["observaciones"].sum()
rz = mc[mc["consumo_kwh"] > 0].assign(r=lambda d: d["facturacion_soles"] / d["consumo_kwh"]).groupby("perfil")["r"].median()
car["S/kWh mediano (kWh>0)"] = rz
TAB_PERFILES = car
car_v = car.rename(columns={"kwh_media": "kWh media", "kwh_mediana": "kWh mediana", "kwh_p25": "kWh P25", "kwh_p75": "kWh P75", "soles_mediana": "S/ mediana",
                            "pct_kwh_cero": "% kWh=0", "pct_BT5B": "% BT5B", "antiguedad_mediana": "antigüedad mediana (años, alta válida)"})
display(car_v.style.format("{:,.1f}", subset=[c for c in car_v.columns if c not in ("provincia_principal", "observaciones")]).format("{:,.0f}", subset=["observaciones"]))
print(f"Antigüedad calculada solo con fechas de alta posteriores a {FECHA_ALTA_DUDOSA_HASTA}; las anteriores se consideran dudosas y se omiten.")

Estabilidad (índice de Rand ajustado entre dos mitades; 1 = idéntico): 0.968


,observaciones,kWh media,kWh mediana,kWh P25,kWh P75,S/ mediana,% kWh=0,% BT5B,"antigüedad mediana (años, alta válida)",provincia_principal,% de la muestra,S/kWh mediano (kWh>0)
perfil,,,,,,,,,,,,
Perfil 1,"41,346",0.8,0.0,0.0,1.0,7.6,58.6,99.9,10.9,SAN ROMAN,27.7,4.3
Perfil 2,"3,233",27.4,3.0,0.0,7.0,0.0,28.0,98.0,11.2,AZANGARO,2.2,0.0
Perfil 3,"48,998",14.0,13.0,7.0,20.0,13.7,0.0,99.9,12.0,SAN ROMAN,32.8,1.2
Perfil 4,"42,505",58.7,54.0,39.0,75.0,55.7,0.0,99.2,13.5,SAN ROMAN,28.4,1.0
Perfil 5,"13,427",405.3,177.0,134.0,304.0,202.3,0.0,94.4,14.7,SAN ROMAN,9.0,1.1


Antigüedad calculada solo con fechas de alta posteriores a 1989-01-01; las anteriores se consideran dudosas y se omiten.


In [19]:
col_perfil = {p: px.colors.qualitative.Set2[i % 8] for i, p in enumerate(PERFILES)}
vis = mc.sample(min(25000, len(mc)), random_state=SEMILLA)
vis = vis.assign(lk=np.log1p(vis["consumo_kwh"]), lf=np.log1p(vis["fact_pos"]))
fig = px.scatter(vis, x="lk", y="lf", color="perfil", category_orders={"perfil": PERFILES}, color_discrete_map=col_perfil, opacity=0.5, render_mode="webgl",
                 hover_data={"consumo_kwh": ":,.1f", "facturacion_soles": ":,.1f", "tarifa": True, "provincia": True, "lk": False, "lf": False},
                 labels={"lk": "log(1 + kWh)", "lf": "log(1 + S/)", "perfil": "Perfil"})
fig.update_layout(title=f"Perfiles de suministro-mes (K-means, k = {K1}; 25 000 puntos de la muestra)", height=520); fig.show()

fig = make_subplots(rows=1, cols=2, subplot_titles=("Consumo medio y mediano por perfil (kWh)", "Distribución de log(1 + kWh) por perfil"), horizontal_spacing=0.12)
fig.add_trace(go.Bar(x=PERFILES, y=car["kwh_media"], name="Media", marker_color=COLOR_DETALLE, hovertemplate="%{x}<br>Media: %{y:,.1f} kWh<extra></extra>"), row=1, col=1)
fig.add_trace(go.Bar(x=PERFILES, y=car["kwh_mediana"], name="Mediana", marker_color="#17becf", hovertemplate="%{x}<br>Mediana: %{y:,.1f} kWh<extra></extra>"), row=1, col=1)
for p in PERFILES:
    s = np.log1p(mc.loc[mc["perfil"] == p, "consumo_kwh"])
    fig.add_trace(go.Box(y=s, name=p, marker_color=col_perfil[p], boxpoints=False, showlegend=False), row=1, col=2)
fig.update_yaxes(title_text="kWh (escala log)", type="log", row=1, col=1); fig.update_yaxes(title_text="log(1 + kWh)", row=1, col=2)
fig.update_xaxes(title_text="Perfil"); fig.update_layout(barmode="group", height=470, legend=dict(orientation="h", y=-0.2)); fig.show()

In [20]:
# ---- Evaluación empresarial de los perfiles de suministro-mes ----
s1 = EV1.loc[K1, "silueta"]
nivel = "estructura razonable" if s1 > 0.5 else ("estructura débil" if s1 > 0.25 else "estructura prácticamente inexistente")
cero_k = [p for p, r in car.iterrows() if r["pct_kwh_cero"] > 50]
sin_fact = [p for p, r in car.iterrows() if r["soles_mediana"] == 0]
print(f"Silueta = {s1:.3f} → {nivel} | estabilidad (ARI) = {ARI1:.3f}.")
print("Perfiles con mayoría de suministros-mes en kWh = 0:", cero_k or "ninguno")
print("Perfiles con facturación mediana = 0 (suministros sin facturar):", sin_fact or "ninguno")
print("""Interpretación prudente: con solo consumo y facturación mensual, los grupos se separan sobre todo por NIVEL de consumo (tramos), más los grupos
definidos por kWh = 0 o por facturación nula. Sirven para dimensionar cuántos suministros-mes caen en cada tramo y cuáles no se están facturando,
pero no prueban que existan "tipos de cliente" distintos: para eso hacen falta series por suministro (identificador persistente).""")

Silueta = 0.552 → estructura razonable | estabilidad (ARI) = 0.968.
Perfiles con mayoría de suministros-mes en kWh = 0: ['Perfil 1']
Perfiles con facturación mediana = 0 (suministros sin facturar): ['Perfil 2']
Interpretación prudente: con solo consumo y facturación mensual, los grupos se separan sobre todo por NIVEL de consumo (tramos), más los grupos
definidos por kWh = 0 o por facturación nula. Sirven para dimensionar cuántos suministros-mes caen en cada tramo y cuáles no se están facturando,
pero no prueban que existan "tipos de cliente" distintos: para eso hacen falta series por suministro (identificador persistente).


## C3. Perfiles de distrito (unidad persistente)

**Unidad:** distrito (clave provincia + distrito). **Datos:** detalle 2023–2025, tarifas con kWh informado.
**Variables:** log del consumo medio por suministro‑mes, coeficiente de variación del consumo individual, proporción de suministros‑mes con kWh = 0, razón S/kWh, proporción de suministros que no son BT5B, **amplitud estacional** (máx−mín de los promedios mensuales sobre su media) y **crecimiento de la cartera** (suministros de los últimos 6 meses vs. los primeros 6).
**Filtro de calidad:** al menos 1 000 suministros‑mes y 24 meses con datos (se informa cuántos distritos se excluyen).
**Método:** estandarización + K‑means; k por silueta (con pocos distritos se usa la silueta completa). Visualización en 2 dimensiones con PCA (solo para dibujar).

In [21]:
cond = f"departamento = 'PUNO' AND tarifa IN {sql_lista(TARIFAS_CON_KWH)}"
zf = cachear("zona_features", f"""
SELECT provincia, distrito, COUNT(*)::BIGINT AS suministros_mes, AVG(consumo_kwh) AS kwh_media, median(consumo_kwh) AS kwh_mediana,
       STDDEV_SAMP(consumo_kwh) / NULLIF(AVG(consumo_kwh), 0) AS cv_kwh, AVG(CASE WHEN consumo_kwh = 0 THEN 1.0 ELSE 0.0 END) AS prop_cero,
       SUM(facturacion_soles) / NULLIF(SUM(consumo_kwh), 0) AS soles_por_kwh, AVG(CASE WHEN tarifa <> 'BT5B' THEN 1.0 ELSE 0.0 END) AS prop_no_bt5b,
       COUNT(DISTINCT periodo)::BIGINT AS periodos
FROM clientes WHERE {cond} GROUP BY 1, 2""")
zm = cachear("zona_mensual", f"""
SELECT provincia, distrito, periodo, COUNT(*)::BIGINT AS n, AVG(consumo_kwh) AS m FROM clientes WHERE {cond} GROUP BY 1, 2, 3""")

def extra(g):
    g = g.sort_values("periodo")
    return pd.Series({"amplitud_estacional": (g["m"].max() - g["m"].min()) / g["m"].mean() if g["m"].mean() > 0 else np.nan,
                      "crecimiento_cartera": g["n"].tail(6).mean() / g["n"].head(6).mean() - 1})
ex = zm.groupby(["provincia", "distrito"]).apply(extra).reset_index()
Z = zf.merge(ex, on=["provincia", "distrito"])
Z["etiqueta"] = Z["distrito"] + " (" + Z["provincia"].str.title() + ")"
elegibles = (Z["suministros_mes"] >= 1000) & (Z["periodos"] >= 24)
print(f"Distritos con datos: {len(Z)} | elegibles (≥1 000 suministros-mes y ≥24 meses): {elegibles.sum()} | excluidos: {(~elegibles).sum()}")
Z = Z[elegibles].dropna().copy()

VARS_Z = {"kwh_media": "log kWh medio", "cv_kwh": "CV del consumo", "prop_cero": "prop. kWh=0", "soles_por_kwh": "S/kWh",
          "prop_no_bt5b": "prop. no BT5B", "amplitud_estacional": "amplitud estacional", "crecimiento_cartera": "crecimiento cartera"}
F = pd.DataFrame({"log kWh medio": np.log(Z["kwh_media"].clip(lower=0.1)), "CV del consumo": np.log1p(Z["cv_kwh"]), "prop. kWh=0": Z["prop_cero"],
                  "S/kWh": Z["soles_por_kwh"].clip(upper=Z["soles_por_kwh"].quantile(0.95)), "prop. no BT5B": Z["prop_no_bt5b"],
                  "amplitud estacional": Z["amplitud_estacional"], "crecimiento cartera": Z["crecimiento_cartera"].clip(Z["crecimiento_cartera"].quantile(0.05), Z["crecimiento_cartera"].quantile(0.95))})
Xz = StandardScaler().fit_transform(F.values)
EV2 = evaluar_k(Xz, range(2, min(7, len(Z) // 5 + 1)), sil_n=len(Z))
display(EV2.style.format({"inercia": "{:,.1f}", "silueta": "{:.3f}", "Davies-Bouldin": "{:.3f}", "Calinski-Harabasz": "{:,.1f}", "tamaño del grupo menor (%)": "{:.1f}"}))
graf_metricas(EV2, "Selección del número de perfiles de distrito", desde=2).show()
K2 = int(EV2["silueta"].idxmax())
print(f"Criterio: k con mayor silueta = {K2} (silueta {EV2.loc[K2, 'silueta']:.3f}).")

Distritos con datos: 108 | elegibles (≥1 000 suministros-mes y ≥24 meses): 102 | excluidos: 6


,inercia,silueta,Davies-Bouldin,Calinski-Harabasz,tamaño del grupo menor (%)
k,,,,,
2,557.8,0.493,0.975,28.0,6.9
3,453.0,0.280,1.436,28.5,8.8
4,368.2,0.254,1.211,30.7,6.9
5,298.2,0.298,1.019,33.8,5.9
6,256.2,0.294,1.065,34.3,5.9


Criterio: k con mayor silueta = 2 (silueta 0.493).


In [22]:
km2 = KMeans(n_clusters=K2, n_init=10, random_state=SEMILLA).fit(Xz)
Z["raw"] = km2.labels_
ord2 = Z.groupby("raw")["kwh_media"].median().sort_values().index.tolist()
Z["grupo"] = Z["raw"].map({r: f"Grupo {i + 1}" for i, r in enumerate(ord2)})
GRUPOS = [f"Grupo {i + 1}" for i in range(K2)]
col_grupo = {g: px.colors.qualitative.Set1[i % 9] for i, g in enumerate(GRUPOS)}

pca = PCA(n_components=2, random_state=SEMILLA).fit(Xz); P = pca.transform(Xz)
Z["PC1"], Z["PC2"] = P[:, 0], P[:, 1]
print(f"PCA (solo para dibujar): PC1 explica {100*pca.explained_variance_ratio_[0]:.1f}% y PC2 {100*pca.explained_variance_ratio_[1]:.1f}% de la variabilidad.")
display(pd.DataFrame(pca.components_.T, index=F.columns, columns=["PC1", "PC2"]).style.format("{:+.2f}"))

fig = px.scatter(Z, x="PC1", y="PC2", color="grupo", category_orders={"grupo": GRUPOS}, color_discrete_map=col_grupo, size="suministros_mes", size_max=35, hover_name="etiqueta",
                 hover_data={"kwh_media": ":.1f", "soles_por_kwh": ":.2f", "prop_cero": ":.1%", "prop_no_bt5b": ":.1%", "amplitud_estacional": ":.2f", "crecimiento_cartera": ":+.1%",
                             "suministros_mes": ":,.0f", "PC1": False, "PC2": False, "grupo": True},
                 labels={"PC1": "Componente principal 1", "PC2": "Componente principal 2", "grupo": "Grupo", "kwh_media": "kWh medio",
                         "soles_por_kwh": "S/kWh", "prop_cero": "% kWh=0", "prop_no_bt5b": "% no BT5B", "amplitud_estacional": "Amplitud estacional",
                         "crecimiento_cartera": "Crecimiento cartera", "suministros_mes": "Suministros-mes"})
fig.update_layout(title=f"Perfiles de distrito (K-means, k = {K2}; tamaño = suministros-mes)", height=540); fig.show()

car2 = Z.groupby("grupo").agg(distritos=("etiqueta", "size"), suministros_mes=("suministros_mes", "sum"), kwh_media_mediana=("kwh_media", "median"),
                              cv_kwh=("cv_kwh", "median"), prop_cero=("prop_cero", "median"), soles_por_kwh=("soles_por_kwh", "median"),
                              prop_no_bt5b=("prop_no_bt5b", "median"), amplitud_estacional=("amplitud_estacional", "median"),
                              crecimiento_cartera=("crecimiento_cartera", "median")).reindex(GRUPOS)
car2["principales distritos (por suministros-mes)"] = [", ".join(Z[Z["grupo"] == g].nlargest(4, "suministros_mes")["etiqueta"]) for g in GRUPOS]
TAB_GRUPOS = car2
display(car2.style.format({"distritos": "{:,.0f}", "suministros_mes": "{:,.0f}", "kwh_media_mediana": "{:,.1f}", "cv_kwh": "{:.2f}", "prop_cero": "{:.1%}", "soles_por_kwh": "{:.2f}",
                           "prop_no_bt5b": "{:.2%}", "amplitud_estacional": "{:.2f}", "crecimiento_cartera": "{:+.1%}"}))

fig = make_subplots(rows=1, cols=2, subplot_titles=("Consumo medio por suministro-mes de cada distrito", "S/kWh observado de cada distrito"), horizontal_spacing=0.1)
for gname in GRUPOS:
    s = Z[Z["grupo"] == gname]
    fig.add_trace(go.Box(y=s["kwh_media"], name=gname, marker_color=col_grupo[gname], boxpoints="all", jitter=0.4, pointpos=0, text=s["etiqueta"],
                         hovertemplate="%{text}<br>%{y:.1f} kWh<extra></extra>", showlegend=False), row=1, col=1)
    fig.add_trace(go.Box(y=s["soles_por_kwh"], name=gname, marker_color=col_grupo[gname], boxpoints="all", jitter=0.4, pointpos=0, text=s["etiqueta"],
                         hovertemplate="%{text}<br>%{y:.2f} S/kWh<extra></extra>", showlegend=False), row=1, col=2)
fig.update_yaxes(title_text="kWh por suministro-mes", type="log", row=1, col=1); fig.update_yaxes(title_text="S/ por kWh", row=1, col=2)
fig.update_xaxes(title_text="Grupo"); fig.update_layout(height=480, title="Distribución de los indicadores dentro de cada grupo de distritos"); fig.show()

s2 = EV2.loc[K2, "silueta"]
print(f"Silueta de los grupos de distritos = {s2:.3f} → " + ("estructura razonable" if s2 > 0.5 else "estructura débil" if s2 > 0.25 else "estructura prácticamente inexistente") + f" (n = {len(Z)} distritos; resultados sensibles al número de distritos).")

PCA (solo para dibujar): PC1 explica 35.1% y PC2 20.7% de la variabilidad.


,PC1,PC2
log kWh medio,-0.56,+0.15
CV del consumo,+0.15,+0.46
prop. kWh=0,+0.28,+0.37
S/kWh,+0.57,-0.16
prop. no BT5B,-0.50,-0.02
amplitud estacional,+0.02,+0.73
crecimiento cartera,-0.08,+0.27


,distritos,suministros_mes,kwh_media_mediana,cv_kwh,prop_cero,soles_por_kwh,prop_no_bt5b,amplitud_estacional,crecimiento_cartera,principales distritos (por suministros-mes)
grupo,,,,,,,,,,
Grupo 1,95,"11,341,004",23.5,5.33,26.0%,1.14,0.40%,0.43,+1.5%,"JULIACA (San Roman), PUNO (Puno), ILAVE (El Collao), AZANGARO (Azangaro)"
Grupo 2,7,"71,087",165.5,2.86,29.8%,0.45,21.26%,0.39,-0.5%,"PLATERIA (Puno), PILCUYO (El Collao), SAN JUAN DEL ORO (Sandia), PATAMBUCO (Sandia)"


Silueta de los grupos de distritos = 0.493 → estructura débil (n = 102 distritos; resultados sensibles al número de distritos).


# RESUMEN EJECUTIVO INTEGRADO

La celda siguiente **recalcula** de forma ligera los indicadores temporales y geográficos clave (para no depender de los otros notebooks) y los combina con los resultados económicos, de distribuciones y de perfiles obtenidos arriba. Todo el texto se genera desde los datos.

In [23]:
# ---------- Temporal (desde resumen_mensual) ----------
res = q("SELECT * FROM resumen ORDER BY periodo")
res["fecha"] = pd.to_datetime(res["periodo"].astype(str) + "01", format="%Y%m%d")
cal_m = pd.date_range(res["fecha"].min(), res["fecha"].max(), freq="MS")
rs = res.set_index("fecha").reindex(cal_m)
faltan_m = [f.strftime("%Y-%m") for f in cal_m.difference(res["fecha"])]
yoy_k = 100 * (rs["consumo_kwh_total"] / rs["consumo_kwh_total"].shift(12) - 1)
yoy_f = 100 * (rs["facturacion_soles_total"] / rs["facturacion_soles_total"].shift(12) - 1)
det_ = rs[rs["granularidad"] == "cliente"]; tt = (det_.index.year - det_.index.year.min()) * 12 + det_.index.month
crec_ps = 100 * (np.exp(12 * stats.linregress(tt, np.log(det_["consumo_kwh_total"] / det_["n_suministros"])).slope) - 1)
crec_n = 100 * (np.exp(12 * stats.linregress(tt, np.log(det_["n_suministros"])).slope) - 1)
mx_m, mn_m = res.loc[res["consumo_kwh_total"].idxmax()], res.loc[res["consumo_kwh_total"].idxmin()]

# ---------- Geográfico (detalle + agregado) ----------
gz = cachear("geo_resumen", """
SELECT provincia, distrito, SUM(kwh) AS kwh, SUM(fact) AS fact, SUM(s)::BIGINT AS suministros_mes FROM (
  SELECT provincia, distrito, SUM(consumo_kwh) AS kwh, SUM(facturacion_soles) AS fact, COUNT(*) AS s FROM clientes WHERE departamento = 'PUNO' GROUP BY 1, 2
  UNION ALL
  SELECT provincia, distrito, SUM(consumo_kwh), SUM(facturacion_soles), SUM(clientes) FROM agregado WHERE departamento = 'PUNO' GROUP BY 1, 2) GROUP BY 1, 2""")
gp_ = gz.groupby("provincia")[["kwh", "fact"]].sum(); gp_["pk"] = 100 * gp_["kwh"] / gp_["kwh"].sum(); gp_["pf"] = 100 * gp_["fact"] / gp_["fact"].sum()
rho_geo = stats.spearmanr(gz["kwh"], gz["fact"])[0]
gz["etq"] = gz["distrito"] + " (" + gz["provincia"].str.title() + ")"
sh5 = 100 * gz["kwh"].nlargest(5).sum() / gz["kwh"].sum()

# ---------- Calidad: ubigeo vs. nombre ----------
dsc = q("""WITH g AS (SELECT provincia, distrito, ubigeo, COUNT(*) AS n FROM clientes GROUP BY 1, 2, 3),
m AS (SELECT provincia, distrito, ubigeo AS modal, ROW_NUMBER() OVER (PARTITION BY provincia, distrito ORDER BY n DESC) AS r FROM g)
SELECT 100.0 * SUM(CASE WHEN g.ubigeo <> m.modal THEN g.n ELSE 0 END) / SUM(g.n) AS pct FROM g JOIN m USING (provincia, distrito) WHERE m.r = 1""").iloc[0, 0]

S = {}   # secciones del resumen
S["Hallazgos temporales"] = [
    f"Se dispone de {len(res)} de {len(cal_m)} meses; sin datos: {faltan_m}. Hay detalle 2023–2025 y agregado 2026 (no comparables en distribuciones).",
    f"Consumo mensual máximo: {mx_m['fecha']:%Y-%m} ({mx_m['consumo_kwh_total']:,.0f} kWh); mínimo: {mn_m['fecha']:%Y-%m} ({mn_m['consumo_kwh_total']:,.0f} kWh).",
    f"Crecimiento anual estimado 2023–2025: suministros {crec_n:+.1f}%, kWh por suministro {crec_ps:+.1f}%.",
    "Variación interanual mediana del consumo total por año: " + "; ".join(f"{a}: {v:+.1f}%" for a, v in yoy_k.groupby(yoy_k.index.year).median().dropna().items())
    + " | facturación: " + "; ".join(f"{a}: {v:+.1f}%" for a, v in yoy_f.groupby(yoy_f.index.year).median().dropna().items()) + ".",
]
S["Hallazgos geográficos"] = [
    "Provincias con más consumo: " + "; ".join(f"{p} {v:.1f}%" for p, v in gp_["pk"].nlargest(3).items()) + ". Con más facturación: " + "; ".join(f"{p} {v:.1f}%" for p, v in gp_["pf"].nlargest(3).items()) + ".",
    f"Distrito con más consumo: {gz.loc[gz['kwh'].idxmax(), 'etq']}; con más facturación: {gz.loc[gz['fact'].idxmax(), 'etq']}. Los 5 mayores distritos concentran {sh5:.1f}% del consumo.",
    f"Los rankings de consumo y facturación por distrito están muy alineados (Spearman = {rho_geo:.2f}).",
]
tt_ = t.copy()
S["Hallazgos económicos"] = [
    "Tarifas que más facturan: " + "; ".join(f"{k} {v:.1f}%" for k, v in tt_["part_fact"].nlargest(3).items()) + ". Tarifas que más consumo informado concentran: " + "; ".join(f"{k} {v:.1f}%" for k, v in tt_["part_kwh"].nlargest(3).items()) + ".",
    f"Tarifas sin kWh informado: {TARIFAS_SIN_KWH}, que suman {tt_.loc[TARIFAS_SIN_KWH, 'part_fact'].sum():.1f}% de la facturación: el consumo total está subestimado.",
    "Mayor consumo medio por suministro-mes (2023–2025): " + "; ".join(f"{k} {v:,.0f} kWh" for k, v in comp["kwh_media"].dropna().nlargest(3).items()) + "; mayor facturación media: " + "; ".join(f"{k} S/ {v:,.0f}" for k, v in comp["fact_media"].nlargest(3).items()) + ".",
    f"Relación consumo–facturación (muestra, positivos): Spearman = {corr_tab.loc['Todas las tarifas (muestra)', 'Spearman']:.2f}; pendiente log-log = {corr_tab.loc['Todas las tarifas (muestra)', 'pendiente log-log']:.2f}.",
]
e1, e2 = est.loc["Consumo kWh · solo > 0 (tarifas con kWh)"], est.loc["Consumo kWh · todas las filas"]
S["Distribuciones y atípicos"] = [
    f"Consumo (todas las filas): media {e2['media']:,.1f} kWh vs. mediana {e2['P50']:,.1f}; asimetría {e2['asimetria']:,.0f}, curtosis (exceso) {e2['curtosis_exceso']:,.0f} → cola derecha extrema.",
    f"Ceros: {100*cal['kwh_cero']/cal['filas']:.1f}% de los suministros-mes con kWh = 0; facturación negativa en {cal['fact_negativa']:,} filas; kWh > 0 con facturación 0 en {cal['kwh_pos_fact_cero']:,} filas.",
    "Mejor ajuste por AIC (BT5B, valores positivos): " + "; ".join(f"{k} → {v[0].index[0]}" for k, v in AJUSTES.items()) + " (ningún modelo es perfecto; ver Q-Q).",
    f"Atípicos por IQR-log (tarifas con kWh): {int(cont['n_iqr_log'].sum()):,} observaciones ({100*cont['n_iqr_log'].sum()/cont['n_pos'].sum():.2f}% de los consumos positivos); por IQR clásico: {100*cont['n_iqr_raw'].sum()/cont['n_pos'].sum():.2f}%. No se califican como error ni fraude.",
]
S["Perfiles de consumo"] = [
    f"`codigo_cliente` {'es' if ID_PERSISTENTE else 'NO es'} identificador persistente (cambia de fecha de alta en {100*estab['cambia_fecha_alta']/estab['en_varios_meses']:.1f}% de los códigos que se repiten): "
    + ("se podrían construir perfiles longitudinales." if ID_PERSISTENTE else "no se construyeron perfiles longitudinales por suministro."),
    f"Perfiles de suministro-mes: k = {K1}, silueta {EV1.loc[K1, 'silueta']:.2f}, estabilidad ARI {ARI1:.2f}; "
    + "; ".join(f"{p}: {r['% de la muestra']:.0f}% de la muestra, mediana {r['kwh_mediana']:,.0f} kWh" for p, r in TAB_PERFILES.iterrows()) + ".",
    f"Perfiles de distrito: k = {K2}, silueta {EV2.loc[K2, 'silueta']:.2f}; " + "; ".join(f"{g}: {int(r['distritos'])} distritos, kWh medio mediano {r['kwh_media_mediana']:,.0f}" for g, r in TAB_GRUPOS.iterrows()) + ".",
]
S["Limitaciones de los datos"] = [
    f"Meses faltantes: {faltan_m}. 2026 es agregado (solo totales y conteos).",
    f"Tarifas sin kWh informado ({', '.join(TARIFAS_SIN_KWH)}): imposible estimar su consumo ni su razón S/kWh.",
    f"`ubigeo` contradice al nombre de provincia/distrito en {dsc:.2f}% de las filas del detalle; se usó el par provincia + distrito como clave territorial.",
    f"`fecha_alta` con valores por defecto: {dud:,} filas ({100*dud/n_cli:.1f}%) con fecha ≤ {FECHA_ALTA_DUDOSA_HASTA}.",
    "Sin identificador persistente no hay seguimiento de suministros individuales; sin coordenadas no hay mapa.",
]
for sec, lineas in S.items():
    print(f"\n■ {sec.upper()}")
    for l_ in lineas: print("  •", l_)


■ HALLAZGOS TEMPORALES
  • Se dispone de 41 de 44 meses; sin datos: ['2024-06', '2024-12', '2025-02']. Hay detalle 2023–2025 y agregado 2026 (no comparables en distribuciones).
  • Consumo mensual máximo: 2026-06 (25,139,146 kWh); mínimo: 2023-03 (17,806,276 kWh).
  • Crecimiento anual estimado 2023–2025: suministros +2.0%, kWh por suministro +2.7%.
  • Variación interanual mediana del consumo total por año: 2024: +3.5%; 2025: +3.6%; 2026: +9.0% | facturación: 2024: +18.4%; 2025: +4.6%; 2026: +1.7%.

■ HALLAZGOS GEOGRÁFICOS
  • Provincias con más consumo: SAN ROMAN 40.8%; PUNO 22.8%; SAN ANTONIO DE PUTINA 7.4%. Con más facturación: SAN ROMAN 36.8%; PUNO 21.6%; SAN ANTONIO DE PUTINA 10.4%.
  • Distrito con más consumo: JULIACA (San Roman); con más facturación: JULIACA (San Roman). Los 5 mayores distritos concentran 70.8% del consumo.
  • Los rankings de consumo y facturación por distrito están muy alineados (Spearman = 0.91).

■ HALLAZGOS ECONÓMICOS
  • Tarifas que más facturan: BT5B 6

In [24]:
# ---------- Recomendaciones empresariales priorizadas (condicionadas a los resultados) ----------
R = []
R.append(("1 · Calidad de datos (urgente, habilita todo lo demás)",
          f"Recuperar los meses faltantes {faltan_m}; solicitar un identificador persistente de suministro; incorporar el kWh de {TARIFAS_SIN_KWH}; "
          f"corregir las filas donde el ubigeo contradice al nombre ({dsc:.2f}%) y reemplazar las fechas de alta por defecto."))
R.append(("2 · Gestión tarifaria y comercial",
          f"Concentrar el análisis comercial en las tarifas que más facturan ({', '.join(tt_['part_fact'].nlargest(3).index)}). Revisar con el área de facturación los casos de kWh > 0 con facturación 0 "
          f"({cal['kwh_pos_fact_cero']:,} filas) y las facturaciones negativas ({cal['fact_negativa']:,}) para confirmar si son ajustes esperados."))
R.append(("3 · Planificación de la demanda",
          f"Planificar con kWh por suministro (crecimiento estimado {crec_ps:+.1f}% anual) y crecimiento de cartera ({crec_n:+.1f}% anual). "
          "La estacionalidad solo es exploratoria con 3 años: no fijar presupuestos mensuales hasta completar la serie."))
R.append(("4 · Priorización territorial",
          f"Priorizar atención y mantenimiento comercial en {', '.join(gp_['pk'].nlargest(3).index)} (concentran {gp_['pk'].nlargest(3).sum():.1f}% del consumo) y vigilar distritos con alta facturación pero bajo kWh informado."))
R.append(("5 · Segmentación de cartera",
          ("Usar los perfiles de distrito como punto de partida de segmentación territorial; los perfiles de suministro-mes equivalen a tramos de consumo (útiles para dimensionar, no para identificar tipos de cliente)."
           if (EV1.loc[K1, 'silueta'] > 0.25 or EV2.loc[K2, 'silueta'] > 0.25) else
           "La estructura de grupos es débil: usar tramos de consumo definidos por negocio en lugar de clusters hasta contar con series por suministro.")))
R.append(("6 · Siguiente análisis",
          "Con un identificador persistente: perfiles longitudinales (curva anual, volatilidad, variación por suministro); con datos de potencia/demanda: análisis de tarifas de media tensión; con límites oficiales: mapa por distrito."))
for t_, txt in R: print(f"► {t_}\n   {txt}\n")

► 1 · Calidad de datos (urgente, habilita todo lo demás)
   Recuperar los meses faltantes ['2024-06', '2024-12', '2025-02']; solicitar un identificador persistente de suministro; incorporar el kWh de ['BT3', 'MT3', 'BT5A', 'MT2', 'BT2']; corregir las filas donde el ubigeo contradice al nombre (0.91%) y reemplazar las fechas de alta por defecto.

► 2 · Gestión tarifaria y comercial
   Concentrar el análisis comercial en las tarifas que más facturan (BT5B, MT4, MT2). Revisar con el área de facturación los casos de kWh > 0 con facturación 0 (109,738 filas) y las facturaciones negativas (18,767) para confirmar si son ajustes esperados.

► 3 · Planificación de la demanda
   Planificar con kWh por suministro (crecimiento estimado +2.7% anual) y crecimiento de cartera (+2.0% anual). La estacionalidad solo es exploratoria con 3 años: no fijar presupuestos mensuales hasta completar la serie.

► 4 · Priorización territorial
   Priorizar atención y mantenimiento comercial en SAN ROMAN, PUNO, SAN 

## Conclusiones del Notebook 3

**1. ¿Qué descubrimos?** — Los resultados numéricos están en el *Resumen ejecutivo* (celdas anteriores). Los cuatro mensajes estructurales: (a) la facturación y el consumo están muy concentrados en pocas tarifas y distritos; (b) varias tarifas no informan kWh; (c) el consumo individual es extremadamente asimétrico y con muchos ceros; (d) `codigo_cliente` no permite seguir suministros, por lo que los perfiles se construyen sobre observaciones y distritos.

**2. ¿Qué indicadores y gráficos lo respaldan?** — Barras y burbujas por tarifa (Parte A); estadísticos, histogramas, KDE, boxplots, ajustes y Q‑Q, tabla de atípicos (Parte B); codo, silueta, dispersión de perfiles y tablas de características (Parte C).

**3. ¿Por qué importa?** — Condiciona cómo medir demanda (kWh no informado), cómo comparar clientes (medianas, no solo promedios), qué casos revisar comercialmente (kWh sin facturación, ajustes negativos, atípicos) y cómo segmentar la cartera.

**4. Acciones/análisis recomendados** — Ver la lista priorizada de la celda anterior.

**5. Limitaciones** — Muestras estratificadas para gráficos y ajustes (los totales son exactos); las pruebas de hipótesis con millones de datos no discriminan (se usaron criterios de información y tamaños de efecto); K‑means supone grupos compactos; los perfiles de suministro‑mes no son perfiles de suministros; los distritos son pocos (n ≈ 100) y las siluetas sensibles; "atípico" no es sinónimo de error ni de fraude.